# B3R — SG Rebuild and Fixes

## Purpose

Rebuild the frozen **SG_v1** architecture (B3) as reusable, tested pipeline code in `src/pipeline/`, correct known issues, and prepare for held-out validation (B4).

## Background

- SG_v1 = **B0 + C1 recovery + adaptive G2**, frozen in B3 (`SG_v1_frozen_config.json`).
- **Erratum (5 Oct 2026):** the Stage-1 gate (`candidate_area_fraction >= 0.85`) was recorded as removed but is embedded in the refinable-component definition. SG_v1 uses **Stage 1 AND Stage 2**. Config corrected; behaviour and results unchanged.

## Plan

| Section | Content | GPU |
|---|---|---|
| 1 | Setup: Drive, repo modules, frozen config, dev100, B3 reference | No |
| 2 | **Cache-based reproduction** of SG_v1 on dev100 (counting logic only) | No |
| 3 | Full end-to-end reproduction from raw images (SAN, A3c, B0, Marigold) | Yes |
| 4 | **SG_v1.1** double-counting fix: diagnostic on dev100, then freeze | No |
| 5 | Dataset and metric fixes (OmniCount points, per-domain queries, mRMSE, class names) | No |
| 6 | Start held-out FSC-147 validation caching | Yes |

## Rules

- No parameter re-tuning on dev100.
- SG_v1 must be reproduced **exactly, image by image**, before any change is made.
- No GT used at inference. FSC-147 test set not accessed.

# 1. Setup

In [1]:
# 1.0 — Mount Google Drive
from google.colab import drive
drive.mount('/content/drive')

Mounted at /content/drive


In [2]:
# ============================================================
# Step 1.1 — Project paths
# ============================================================

from pathlib import Path

PROJECT_ROOT = Path("/content/drive/MyDrive/MSc_Project_ZeroShot_Counting")
RESULTS_ROOT = PROJECT_ROOT / "results"

DEV100_CSV = RESULTS_ROOT / "B1_experiments" / "subsets" / "FSC147_val_dev_100.csv"

B3_DIR = RESULTS_ROOT / "B3_B0_B2_M_Geometry_Integration"
SG_V1_CONFIG_FILE = B3_DIR / "metadata" / "SG_v1_frozen_config.json"
B3_REFERENCE_FILE = B3_DIR / "tables" / "B3_step3F_frozen_architectures_per_image.csv"

B3R_DIR = RESULTS_ROOT / "B3R_SG_Rebuild_and_Fixes"
B3R_S2_DIR = B3R_DIR / "section2_cache_reproduction"
B3R_S2_DIR.mkdir(parents=True, exist_ok=True)

for p in [DEV100_CSV, SG_V1_CONFIG_FILE, B3_REFERENCE_FILE]:
    assert p.exists(), f"Missing: {p}"

print("PROJECT_ROOT :", PROJECT_ROOT)
print("B3R output   :", B3R_DIR)
print("Paths        : PASS")

PROJECT_ROOT : /content/drive/MyDrive/MSc_Project_ZeroShot_Counting
B3R output   : /content/drive/MyDrive/MSc_Project_ZeroShot_Counting/results/B3R_SG_Rebuild_and_Fixes
Paths        : PASS


In [3]:
# ============================================================
# Step 1.2 — Clone repo and import pipeline modules
# ============================================================

import subprocess
import sys

REPO_URL = "https://github.com/paulmcchan/Surrey-MScProject-Zero-Shot-Object-Counting.git"
REPO_DIR = Path("/content/Surrey-MScProject-Zero-Shot-Object-Counting")

!rm -rf "{REPO_DIR}"
!git clone -q "{REPO_URL}" "{REPO_DIR}"

if str(REPO_DIR) not in sys.path:
    sys.path.insert(0, str(REPO_DIR))

REPO_COMMIT = subprocess.check_output(
    ["git", "-C", str(REPO_DIR), "rev-parse", "HEAD"], text=True
).strip()

import importlib
import src.pipeline.io_cache as io_cache
import src.pipeline.sg as sg
importlib.reload(io_cache)
importlib.reload(sg)

import numpy, scipy, sklearn, pandas
LIB_VERSIONS = {
    "python": sys.version.split()[0],
    "numpy": numpy.__version__,
    "scipy": scipy.__version__,
    "sklearn": sklearn.__version__,
    "pandas": pandas.__version__,
}

print("Repo commit :", REPO_COMMIT)
for k, v in LIB_VERSIONS.items():
    print(f"{k:<8}: {v}")
print("Modules     : src.pipeline.io_cache, src.pipeline.sg — PASS")

Repo commit : 785d0b59c8bff918d9dc8861b4a5cb6113045e8e
python  : 3.13.15
numpy   : 2.1.3
scipy   : 1.16.3
sklearn : 1.6.1
pandas  : 2.2.3
Modules     : src.pipeline.io_cache, src.pipeline.sg — PASS


In [4]:
# ============================================================
# Step 1.3 — Frozen config, dev100 and B3 reference
# ============================================================

import json
import pandas as pd

with open(SG_V1_CONFIG_FILE) as f:
    sg_v1_config_raw = json.load(f)

assert sg_v1_config_raw["architecture_id"] == "SG_v1"
assert "erratum" in sg_v1_config_raw, "Apply the B3 erratum first."

SG_V1_CFG = sg.SGConfig.from_frozen_json(SG_V1_CONFIG_FILE, variant="v1")

dev100_df = pd.read_csv(DEV100_CSV)
assert len(dev100_df) == 100
assert dev100_df["dataset_index"].is_unique

reference_df = pd.read_csv(B3_REFERENCE_FILE)
assert len(reference_df) == 100
assert set(reference_df["dataset_index"]) == set(dev100_df["dataset_index"])

print("SG_v1 config (as used by src.pipeline.sg):")
for k, v in SG_V1_CFG.to_dict().items():
    print(f"  {k:<26}: {v}")

print("\ndev100 images      :", len(dev100_df))
print("B3 reference rows  :", len(reference_df))
print("Reference columns  :", list(reference_df.columns))

SG_v1 config (as used by src.pipeline.sg):
  candidate_quantile        : 0.75
  satellite_parent_fraction : 0.001
  stage1_threshold          : 0.85
  stage2_threshold          : 5.0
  correction_weight         : 1.0
  kmeans_k                  : 2
  kmeans_random_state       : 0
  kmeans_n_init             : 10
  variant                   : v1

dev100 images      : 100
B3 reference rows  : 100
Reference columns  : ['dataset_index', 'image_id', 'category', 'density_stratum', 'gt_count', 'S_count', 'SG_w1.00_count', 'B0_count', 'SG_count', 'SDG_count']


# 2. Cache-based reproduction of SG_v1

## Purpose

Prove that `src/pipeline/sg.py` reproduces the frozen SG_v1 **counting logic** exactly, using the frozen dev100 caches (no model inference):

- B0 masks (B2 cache)
- A3c masks (ABC artefacts)
- Marigold depth (M1 cache)

All C1 components, B0 coverage, split candidates, k-means depth splits, G2 retention, gates and counts are **recomputed** from these inputs.

## Pass criteria

1. `B0_count`, `S_count` and `SG_count` match `B3_step3F_frozen_architectures_per_image.csv` on **all 100 images**.
2. Structural totals match the frozen notebooks: 2,554 C1 components; 1,215 C1 recovery components; 699 split candidates; 6,522 raw candidate fragments; Stage 1 ON in 57 images; Stage 1+2 ON in 16 images; 1,205 geometry extra units used.
3. Per-image raw sub-component and candidate counts match the M1 Step-7B split cache.
4. Metrics reproduce: B0 MAE 80.69, S MAE 72.00, SG MAE 61.93.

In [ ]:
# ============================================================
# Step 2.1 — Verify all frozen dev100 caches exist
# ============================================================

missing = []
for row in dev100_df.itertuples(index=False):
    for kind, path in io_cache.cache_paths(row.dataset_index, row.image_id).items():
        if not path.exists():
            missing.append((row.dataset_index, row.image_id, kind, str(path)))

assert not missing, f"Missing cache files ({len(missing)}): {missing[:5]}"

print("Cache types checked : b0_masks, a3c_masks, depth, m1_split_labels")
print("Files expected      :", 4 * len(dev100_df))
print("Missing             : 0 — PASS")

Cache types checked : b0_masks, a3c_masks, depth, m1_split_labels
Files expected      : 400
Missing             : 0 — PASS


In [ ]:
# ============================================================
# Step 2.2 — Recompute SG_v1 for all dev100 images
# ============================================================

import time
from tqdm.auto import tqdm

image_rows = []
component_rows = []
t0 = time.time()

for row in tqdm(dev100_df.itertuples(index=False), total=len(dev100_df)):
    paths = io_cache.cache_paths(row.dataset_index, row.image_id)

    b0_masks, b0_meta = io_cache.load_b0_masks(paths["b0_masks"])
    a3c_mask, _ = io_cache.load_a3c_mask(paths["a3c_masks"])
    depth = io_cache.load_depth(paths["depth"])
    m1 = io_cache.load_m1_split_labels(paths["m1_split_labels"])

    summary, components = sg.compute_sg_image(b0_masks, a3c_mask, depth, SG_V1_CFG)

    image_rows.append({
        "dataset_index": row.dataset_index,
        "image_id": row.image_id,
        "category": row.category,
        "density_stratum": row.density_stratum,
        "gt_count": row.gt_count,
        **summary,
        "M1_original_num_components": m1["original_num_components"],
        "M1_raw_num_subcomponents": m1["raw_num_subcomponents"],
        "M1_num_candidate_components": m1["num_candidate_components"],
    })
    for comp in components:
        component_rows.append({"dataset_index": row.dataset_index, **comp})

repro_df = pd.DataFrame(image_rows).sort_values("dataset_index").reset_index(drop=True)
repro_components_df = pd.DataFrame(component_rows)

print(f"Images processed : {len(repro_df)}")
print(f"Components       : {len(repro_components_df)}")
print(f"Runtime          : {time.time() - t0:.1f} s")

  0%|          | 0/100 [00:00<?, ?it/s]

Images processed : 100
Components       : 2554
Runtime          : 254.3 s


In [ ]:
# ============================================================
# Step 2.3 — Image-by-image comparison with B3 reference
# ============================================================

import numpy as np

cmp_df = repro_df.merge(
    reference_df[["dataset_index", "B0_count", "S_count", "SG_count"]],
    on="dataset_index",
    suffixes=("", "_ref"),
    validate="one_to_one",
)
assert len(cmp_df) == 100

checks = {}
for col in ["B0_count", "S_count", "SG_count"]:
    match = np.isclose(cmp_df[col], cmp_df[f"{col}_ref"], rtol=0, atol=1e-9)
    checks[col] = int(match.sum())
    cmp_df[f"{col}_match"] = match

print("Image-level matches (out of 100):")
for col, n in checks.items():
    print(f"  {col:<9}: {n}/100  {'PASS' if n == 100 else 'FAIL'}")

mismatch_df = cmp_df[
    ~(cmp_df["B0_count_match"] & cmp_df["S_count_match"] & cmp_df["SG_count_match"])
]
if len(mismatch_df):
    print("\nMismatched images:")
    display(mismatch_df[[
        "dataset_index", "image_id", "density_stratum",
        "B0_count", "B0_count_ref", "S_count", "S_count_ref",
        "SG_count", "SG_count_ref", "stage1_on", "stage2_on",
        "G2_extra_refinable_v1",
    ]])

Image-level matches (out of 100):
  B0_count : 100/100  PASS
  S_count  : 100/100  PASS
  SG_count : 100/100  PASS


In [ ]:
# ============================================================
# Step 2.4 — Structural totals and M1 split-cache cross-check
# ============================================================

EXPECTED_TOTALS = {
    "C1 components":              ("C1_components", 2554),
    "C1 recovery components":     ("C1_recovery", 1215),
    "Split candidates":           ("split_candidates", 699),
    "Stage-1 ON images":          ("stage1_on", 57),
    "Stage-1+2 ON images":        ("stage2_on", 16),
}

total_checks = {}
print("Structural totals:")
for label, (col, expected) in EXPECTED_TOTALS.items():
    observed = int(repro_df[col].sum())
    total_checks[label] = observed == expected
    print(f"  {label:<26}: {observed:>6}  (expected {expected})  "
          f"{'PASS' if observed == expected else 'FAIL'}")

# Raw candidate fragments (M1 Step 7C/7D: 6522)
raw_candidate_fragments = int(
    repro_components_df.loc[repro_components_df["split_candidate"], "raw_fragments"].sum()
)
total_checks["Raw candidate fragments"] = raw_candidate_fragments == 6522
print(f"  {'Raw candidate fragments':<26}: {raw_candidate_fragments:>6}  (expected 6522)  "
      f"{'PASS' if raw_candidate_fragments == 6522 else 'FAIL'}")

# Geometry extra units actually used by SG_v1
g_used = int(repro_df["G_effective"].sum())
total_checks["Geometry units used"] = g_used == 1205
print(f"  {'Geometry units used':<26}: {g_used:>6}  (expected 1205)  "
      f"{'PASS' if g_used == 1205 else 'FAIL'}")

# Per-image M1 cross-check
m1_checks = {
    "components": (repro_df["C1_components"] == repro_df["M1_original_num_components"]),
    "raw_subcomponents": (repro_df["raw_subcomponents"] == repro_df["M1_raw_num_subcomponents"]),
    "candidates": (repro_df["split_candidates"] == repro_df["M1_num_candidate_components"]),
}
print("\nPer-image M1 Step-7B cache cross-check (out of 100):")
for k, ok in m1_checks.items():
    print(f"  {k:<18}: {int(ok.sum())}/100  {'PASS' if ok.all() else 'FAIL'}")

if not m1_checks["raw_subcomponents"].all():
    display(repro_df.loc[~m1_checks["raw_subcomponents"], [
        "dataset_index", "image_id", "raw_subcomponents", "M1_raw_num_subcomponents",
    ]])

Structural totals:
  C1 components             :   2554  (expected 2554)  PASS
  C1 recovery components    :   1215  (expected 1215)  PASS
  Split candidates          :    699  (expected 699)  PASS
  Stage-1 ON images         :     57  (expected 57)  PASS
  Stage-1+2 ON images       :     16  (expected 16)  PASS
  Raw candidate fragments   :   6522  (expected 6522)  PASS
  Geometry units used       :   1205  (expected 1205)  PASS

Per-image M1 Step-7B cache cross-check (out of 100):
  components        : 100/100  PASS
  raw_subcomponents : 100/100  PASS
  candidates        : 100/100  PASS


In [ ]:
# ============================================================
# Step 2.5 — Metric reproduction (overall and by stratum)
# ============================================================

def count_metrics(pred, gt):
    err = np.asarray(pred, float) - np.asarray(gt, float)
    return {
        "MAE": float(np.abs(err).mean()),
        "RMSE": float(np.sqrt((err ** 2).mean())),
        "mean_signed_error": float(err.mean()),
    }

metric_rows = []
for system, col in [("B0", "B0_count"), ("S", "S_count"), ("SG_v1", "SG_count")]:
    metric_rows.append({"system": system, **count_metrics(repro_df[col], repro_df["gt_count"])})
metrics_df = pd.DataFrame(metric_rows)
display(metrics_df.round(4))

EXPECTED_MAE = {"B0": 80.69, "S": 72.00, "SG_v1": 61.93}
mae_checks = {
    s: abs(float(metrics_df.loc[metrics_df["system"] == s, "MAE"].iloc[0]) - v) < 0.005
    for s, v in EXPECTED_MAE.items()
}
for s, ok in mae_checks.items():
    print(f"{s:<6} MAE matches frozen value {EXPECTED_MAE[s]:.2f}: {'PASS' if ok else 'FAIL'}")

STRATA = ["S1_0_20", "S2_20_40", "S3_40_60", "S4_60_80", "S5_80_95", "S6_95_100"]
by_stratum = (
    repro_df.assign(
        B0_abs=lambda d: (d["B0_count"] - d["gt_count"]).abs(),
        S_abs=lambda d: (d["S_count"] - d["gt_count"]).abs(),
        SG_abs=lambda d: (d["SG_count"] - d["gt_count"]).abs(),
    )
    .groupby("density_stratum")[["B0_abs", "S_abs", "SG_abs"]]
    .mean()
    .reindex(STRATA)
    .rename(columns={"B0_abs": "B0_MAE", "S_abs": "S_MAE", "SG_abs": "SG_v1_MAE"})
)
print("\nMAE by density stratum:")
display(by_stratum.round(2))

,system,MAE,RMSE,mean_signed_error
0,B0,80.69,270.2339,-77.47
1,S,72.00,262.2353,-65.32
2,SG_v1,61.93,246.5852,-53.27


B0     MAE matches frozen value 80.69: PASS
S      MAE matches frozen value 72.00: PASS
SG_v1  MAE matches frozen value 61.93: PASS

MAE by density stratum:


,B0_MAE,S_MAE,SG_v1_MAE
density_stratum,,,
S1_0_20,5.15,4.55,5.95
S2_20_40,6.55,5.60,6.80
S3_40_60,14.95,8.95,8.70
S4_60_80,34.30,24.15,22.40
S5_80_95,62.10,44.60,40.60
S6_95_100,622.90,588.90,491.00


In [ ]:
# ============================================================
# Step 2.6 — Save artefacts and Section 2 verdict
# ============================================================

from datetime import datetime, timezone

all_pass = (
    all(n == 100 for n in checks.values())
    and all(total_checks.values())
    and all(ok.all() for ok in m1_checks.values())
    and all(mae_checks.values())
)

repro_df.to_csv(B3R_S2_DIR / "B3R_s2_SG_v1_per_image.csv", index=False)
repro_components_df.to_csv(B3R_S2_DIR / "B3R_s2_SG_v1_components.csv", index=False)
metrics_df.to_csv(B3R_S2_DIR / "B3R_s2_SG_v1_metrics.csv", index=False)
by_stratum.to_csv(B3R_S2_DIR / "B3R_s2_SG_v1_metrics_by_stratum.csv")

metadata = {
    "section": "B3R Section 2 — cache-based SG_v1 reproduction",
    "date_utc": datetime.now(timezone.utc).isoformat(timespec="seconds"),
    "repo_commit": REPO_COMMIT,
    "library_versions": LIB_VERSIONS,
    "sg_config": SG_V1_CFG.to_dict(),
    "inputs": "frozen dev100 caches: B2 B0 masks, ABC A3c masks, M1 depth",
    "image_matches": checks,
    "structural_totals_pass": total_checks,
    "m1_crosscheck_pass": {k: bool(v.all()) for k, v in m1_checks.items()},
    "mae_pass": mae_checks,
    "all_pass": bool(all_pass),
    "gt_used_for_inference": False,
    "test_set_accessed": False,
}
with open(B3R_S2_DIR / "B3R_s2_metadata.json", "w") as f:
    json.dump(metadata, f, indent=2)

print("=" * 80)
print("B3R SECTION 2 — CACHE-BASED SG_v1 REPRODUCTION")
print("=" * 80)
print("Saved to:", B3R_S2_DIR)
print("\nVERDICT:", "PASS — src.pipeline.sg reproduces SG_v1 exactly"
      if all_pass else "FAIL — inspect mismatches above before proceeding")

B3R SECTION 2 — CACHE-BASED SG_v1 REPRODUCTION
Saved to: /content/drive/MyDrive/MSc_Project_ZeroShot_Counting/results/B3R_SG_Rebuild_and_Fixes/section2_cache_reproduction

VERDICT: PASS — src.pipeline.sg reproduces SG_v1 exactly


# 3. End-to-end reproduction from raw images (GPU)

## Purpose

Section 2 proved the **counting logic** on frozen caches. This section proves the **model stages** regenerate those inputs from raw images, using the new repo modules:

| Stage | Module | Frozen reference | Expected |
|---|---|---|---|
| SAN target score map | `src/pipeline/semantic.py` | ABC SAN cache | identical or numerically negligible difference |
| A3c mask (90th percentile) | `semantic.a3c_mask` | ABC A3c masks | identical |
| B0 AMG masks | `src/pipeline/b0.py` | B2 B0 mask cache | identical mask sets |
| Marigold depth | `src/pipeline/depth.py` | M1 depth cache | bit-exact (M1 verified this on T4) |
| SG_v1 / SG_v1.1 counts | `src/pipeline/sg.py` | B3 reference / Section 4 | 100/100 |

## Runtime

- **T4 GPU** required. Change the runtime type, then run **Section 1** first, then this section.
- Installs take ~10–15 min (detectron2 builds from source). The dev100 loop takes ~15–20 min.
- If Colab asks to **restart the session** after an install, restart, re-run Section 1, and continue from the next Section-3 cell. Installed packages persist across a session restart.

## Rule

No parameter changes. Any difference is reported, not tuned away.

In [ ]:
# ============================================================
# Step 3.1 — GPU check + install SAM2 at the frozen commit
# ============================================================

import subprocess
import torch

assert torch.cuda.is_available(), "No GPU — switch the runtime to T4."
DEVICE = "cuda"
print("GPU   :", torch.cuda.get_device_name(0))
print("Torch :", torch.__version__, "| CUDA", torch.version.cuda)

import src.pipeline.b0 as b0

# Cloned as "sam2_repo" (not "sam2") so that `import sam2` can never pick up
# the repository root as a namespace package when the working dir is /content.
SAM2_ROOT = Path("/content/sam2_repo")
FROZEN_SAM2_COMMIT = b0.FROZEN_SAM2_COMMIT

%cd /content
!rm -rf /content/sam2_repo
!git clone -q https://github.com/facebookresearch/sam2.git /content/sam2_repo
!git -C /content/sam2_repo checkout -q {FROZEN_SAM2_COMMIT}

sam2_commit = subprocess.check_output(
    ["git", "-C", str(SAM2_ROOT), "rev-parse", "HEAD"], text=True
).strip()
assert sam2_commit == b0.FROZEN_SAM2_COMMIT, sam2_commit

%cd /content/sam2_repo
!pip install -q -e .
%cd /content

print("\nSAM2 commit :", sam2_commit, "(frozen) — PASS")

GPU   : Tesla T4
Torch : 2.11.0+cu130 | CUDA 13.0
/content
/content/sam2_repo
  Installing build dependencies ... done
  Checking if build backend supports build_editable ... done
  Getting requirements to build editable ... done
  Preparing editable metadata (pyproject.toml) ... done
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 42.2/42.2 kB 2.9 MB/s eta 0:00:00
  Preparing metadata (setup.py) ... done
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 168.8/168.8 kB 10.7 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 129.6/129.6 kB 14.3 MB/s eta 0:00:00
  Building editable for SAM-2 (pyproject.toml) ... done
/content

SAM2 commit : 2b90b9f5ceec907a1c18123530e92e794ad901a4 (frozen) — PASS


In [ ]:
# ============================================================
# Step 3.2 — Install SAN + detectron2 (as ABC Steps 2A–2C)
# ============================================================
#
# detectron2 pinned to the commit resolved in the ABC run.
# ============================================================

SAN_ROOT = Path("/content/SAN")
DETECTRON2_COMMIT = "1e3e13bbf607b54f62205c4c33922521822fb298"

%cd /content
!rm -rf /content/SAN
!git clone -q https://github.com/MendelXu/SAN.git /content/SAN

!pip install -q cython scipy shapely timm h5py submitit scikit-image wandb setuptools fvcore tabulate regex opencv-python "open_clip_torch==2.16.0"

!pip uninstall -y -q detectron2
!python -m pip install -q "git+https://github.com/facebookresearch/detectron2.git@{DETECTRON2_COMMIT}"

# Restore the versions ABC ran with. Colab's newer tensorboard pulls
# protobuf to 7.x during the detectron2 install, which breaks `import wandb`
# (imported by `import san`). ABC ran with protobuf 3.20.3 and iopath 0.1.10.
!pip install -q "protobuf==3.20.3" "iopath==0.1.10"

san_commit = subprocess.check_output(
    ["git", "-C", str(SAN_ROOT), "rev-parse", "HEAD"], text=True
).strip()
print("\nSAN repo commit   :", san_commit)
print("detectron2 commit :", DETECTRON2_COMMIT)

/content
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 50.2/50.2 kB 4.4 MB/s eta 0:00:00
  Preparing metadata (setup.py) ... done
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 42.8/42.8 kB 1.8 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 1.5/1.5 MB 10.5 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 76.0/76.0 kB 3.0 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 25.3/25.3 MB 77.3 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 228.5/228.5 kB 24.1 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 162.1/162.1 kB 18.1 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 44.8/44.8 kB 4.8 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 62.8/62.8 kB 6.9 MB/s eta 0:00:00
ERROR: pip's dependency resolver does not currently take into account all the packages that are installed. This behaviour is the source of the following dependency conflicts.
googleapis-common-protos 1.75.5 requires protobuf<8.0.0,>=6.33.

In [ ]:
# ============================================================
# Step 3.3 — Install Marigold dependencies (versions frozen in M1)
# ============================================================

!pip install -q "accelerate==1.14.0" "diffusers==0.40.0" "transformers==5.16.1"

import importlib.metadata as md_meta

MODEL_ENV = {}
for pkg in ["torch", "diffusers", "transformers", "accelerate",
            "detectron2", "open_clip_torch", "timm", "SAM-2",
            "opencv-python", "numpy", "scipy", "scikit-learn", "Pillow"]:
    try:
        MODEL_ENV[pkg] = md_meta.version(pkg)
    except md_meta.PackageNotFoundError:
        MODEL_ENV[pkg] = "not installed"

MODEL_ENV["sam2_commit"] = sam2_commit
MODEL_ENV["san_commit"] = san_commit
MODEL_ENV["detectron2_commit"] = DETECTRON2_COMMIT
MODEL_ENV["gpu"] = torch.cuda.get_device_name(0)

for k, v in MODEL_ENV.items():
    print(f"{k:<18}: {v}")

print("\nIf Colab asks to restart the session: restart, re-run Section 1, "
      "then continue from Step 3.4 (do not re-run the installs).")

   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 389.2/389.2 kB 15.1 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 12.1/12.1 MB 68.3 MB/s eta 0:00:00
torch             : 2.11.0+cu130
diffusers         : 0.40.0
transformers      : 5.16.1
accelerate        : 1.14.0
detectron2        : 0.6
open_clip_torch   : 2.16.0
timm              : 1.0.30
SAM-2             : 1.0
opencv-python     : 5.0.0.93
numpy             : 2.1.3
scipy             : 1.16.3
scikit-learn      : 1.6.1
Pillow            : 11.3.0
sam2_commit       : 2b90b9f5ceec907a1c18123530e92e794ad901a4
san_commit        : e19262d1a23992fc2cef934d6756b89ff50fe5c3
detectron2_commit : 1e3e13bbf607b54f62205c4c33922521822fb298
gpu               : Tesla T4

If Colab asks to restart the session: restart, re-run Section 1, then continue from Step 3.4 (do not re-run the installs).


In [ ]:

# ============================================================
# Step 3.3b — Pin ABC package versions + verify imports
# ============================================================
#
# Why: during the detectron2 install, Colab's newer tensorboard pulled
# protobuf to 7.x. wandb (imported by `import san`) cannot load under
# protobuf 7 -> ImportError in Step 3.6. ABC ran with protobuf 3.20.3
# and iopath 0.1.10, so both are pinned back here.
#
# The import test runs in a FRESH Python process, so it reflects what
# the notebook will see after the session restart.
# ============================================================

!pip install -q "protobuf==3.20.3" "iopath==0.1.10"

import importlib.metadata as md_meta
import subprocess
import sys

for pkg in ["protobuf", "iopath", "wandb", "open_clip_torch", "detectron2",
            "SAM-2", "diffusers", "transformers", "accelerate", "torch"]:
    try:
        print(f"{pkg:<16}: {md_meta.version(pkg)}")
    except md_meta.PackageNotFoundError:
        print(f"{pkg:<16}: not installed")

assert md_meta.version("protobuf") == "3.20.3", "protobuf pin failed"
assert md_meta.version("iopath") == "0.1.10", "iopath pin failed"

IMPORT_TEST = r"""
import sys
sys.path.insert(0, "/content/SAN")
import google.protobuf, wandb, open_clip, detectron2
import san
from sam2.build_sam import build_sam2
from diffusers import MarigoldDepthPipeline
print("protobuf", google.protobuf.__version__)
print("ALL IMPORTS OK")
"""
result = subprocess.run(
    [sys.executable, "-c", IMPORT_TEST],
    cwd="/content", capture_output=True, text=True,
)
print("\nFresh-process import test:")
print(result.stdout.strip())
if result.returncode != 0:
    print(result.stderr[-3000:])
    raise RuntimeError("Import test failed — do not continue.")

print("\nNEXT: Runtime -> Restart session, re-run Section 1, "
      "then continue from Step 3.4 (do not re-run 3.1-3.3b).")


protobuf        : 3.20.3
iopath          : 0.1.10
wandb           : 0.25.0
open_clip_torch : 2.16.0
detectron2      : 0.6
SAM-2           : 1.0
diffusers       : 0.40.0
transformers    : 5.16.1
accelerate      : 1.14.0
torch           : 2.11.0+cu130

Fresh-process import test:
protobuf 3.20.3
ALL IMPORTS OK

NEXT: Runtime -> Restart session, re-run Section 1, then continue from Step 3.4 (do not re-run 3.1-3.3b).


In [ ]:
# ============================================================
# Step 3.4 — Paths, modules and frozen reference data
# ============================================================

import importlib
import json
import subprocess
import sys
import time

import numpy as np
import pandas as pd
import torch
from PIL import Image

import importlib.metadata as md_meta
assert md_meta.version("protobuf") == "3.20.3", (
    "protobuf is not 3.20.3 — run Step 3.3b, restart the session, re-run Section 1."
)
import google.protobuf
assert google.protobuf.__version__ == "3.20.3", (
    "protobuf 3.20.3 is installed but a different version is still loaded in memory — "
    "restart the session (Runtime -> Restart session) and re-run Section 1."
)

if "DEVICE" not in globals():
    DEVICE = "cuda"
# Record the environment as it actually is after the restart
MODEL_ENV = {}
for pkg in ["torch", "diffusers", "transformers", "accelerate", "detectron2",
            "open_clip_torch", "timm", "SAM-2", "protobuf", "iopath", "wandb",
            "opencv-python", "numpy", "scipy", "scikit-learn", "Pillow"]:
    try:
        MODEL_ENV[pkg] = md_meta.version(pkg)
    except md_meta.PackageNotFoundError:
        MODEL_ENV[pkg] = "not installed"
MODEL_ENV["sam2_commit"] = subprocess.check_output(
    ["git", "-C", "/content/sam2_repo", "rev-parse", "HEAD"], text=True).strip()
MODEL_ENV["san_commit"] = subprocess.check_output(
    ["git", "-C", "/content/SAN", "rev-parse", "HEAD"], text=True).strip()
MODEL_ENV["detectron2_commit"] = "1e3e13bbf607b54f62205c4c33922521822fb298"
MODEL_ENV["gpu"] = torch.cuda.get_device_name(0)
MODEL_ENV["cuda"] = torch.version.cuda
print("Environment recorded:")
for k, v in MODEL_ENV.items():
    print(f"  {k:<18}: {v}")

SAN_ROOT = Path("/content/SAN")
FSC147_IMAGE_DIR = PROJECT_ROOT / "datasets" / "FSC147" / "raw" / "images_384_VarV2"
SAM2_CHECKPOINT = PROJECT_ROOT / "Checkpoints" / "SAM2" / "sam2.1_hiera_small.pt"
SAN_CHECKPOINT_DRIVE = PROJECT_ROOT / "Checkpoints" / "SAN" / "san_vit_b_16.pth"

B3R_S3_DIR = B3R_DIR / "section3_end_to_end"
B3R_S3_FRESH = B3R_S3_DIR / "fresh_dev100_cache"
B3R_S3_DIR.mkdir(parents=True, exist_ok=True)

# ------------------------------------------------------------
# Make the SAM2 editable install visible in THIS kernel.
# `pip install -e` registers the package for NEW Python processes; a
# kernel that was not restarted after Step 3.1 cannot see it
# (Step 3.3b's fresh-process test passes, but this kernel would fail
# with "No module named 'sam2'"). Adding the repo root to sys.path is
# exactly what the editable install does, so behaviour is identical.
# ------------------------------------------------------------
SAM2_REPO = Path("/content/sam2_repo")
assert (SAM2_REPO / "sam2" / "__init__.py").exists(), "SAM2 repo missing — run Step 3.1."
if str(SAM2_REPO) not in sys.path:
    sys.path.insert(0, str(SAM2_REPO))
importlib.invalidate_caches()

import sam2
from sam2.build_sam import build_sam2  # noqa: F401  (import check)
assert Path(sam2.__file__).resolve().parent == (SAM2_REPO / "sam2").resolve(), sam2.__file__
print("sam2 imported from:", Path(sam2.__file__).parent)

import src.pipeline.b0 as b0
import src.pipeline.semantic as semantic
import src.pipeline.depth as depth_mod
import src.pipeline.io_cache as io_cache
import src.pipeline.sg as sg
for m in (b0, semantic, depth_mod, io_cache, sg):
    importlib.reload(m)

assert FSC147_IMAGE_DIR.exists(), FSC147_IMAGE_DIR
assert SAM2_CHECKPOINT.exists(), SAM2_CHECKPOINT

# Frozen references
ref_v1 = pd.read_csv(B3_REFERENCE_FILE)[["dataset_index", "B0_count", "S_count", "SG_count"]]
ref_v11 = pd.read_csv(
    B3R_DIR / "section4_SG_v1_1" / "B3R_s4_SG_v1_1_per_image.csv"
)[["dataset_index", "SG_count"]].rename(columns={"SG_count": "SG_v1_1_count"})
reference_s3 = ref_v1.merge(ref_v11, on="dataset_index", validate="one_to_one")
assert len(reference_s3) == 100

SG_V11_CFG = sg.SGConfig.from_frozen_json(SG_V1_CONFIG_FILE, variant="v1.1")

print("Modules       : b0, semantic, depth, io_cache, sg — loaded")
print("Repo commit   :", REPO_COMMIT)
print("Reference rows:", len(reference_s3))

Environment recorded:
  torch             : 2.11.0+cu130
  diffusers         : 0.40.0
  transformers      : 5.16.1
  accelerate        : 1.14.0
  detectron2        : 0.6
  open_clip_torch   : 2.16.0
  timm              : 1.0.30
  SAM-2             : 1.0
  protobuf          : 3.20.3
  iopath            : 0.1.10
  wandb             : 0.25.0
  opencv-python     : 5.0.0.93
  numpy             : 2.1.3
  scipy             : 1.16.3
  scikit-learn      : 1.6.1
  Pillow            : 11.3.0
  sam2_commit       : 2b90b9f5ceec907a1c18123530e92e794ad901a4
  san_commit        : e19262d1a23992fc2cef934d6756b89ff50fe5c3
  detectron2_commit : 1e3e13bbf607b54f62205c4c33922521822fb298
  gpu               : Tesla T4
  cuda              : 13.0
sam2 imported from: /content/sam2_repo/sam2
Modules       : b0, semantic, depth, io_cache, sg — loaded
Repo commit   : 1823232c080b34b0abb875b6e46514471cc3f74d
Reference rows: 100


In [ ]:
# ============================================================
# Step 3.5 — CPU pre-check: cached SAN maps -> A3c function
# ============================================================
#
# Isolates the A3c thresholding from SAN inference: applying
# semantic.a3c_mask to the FROZEN SAN maps must reproduce the
# FROZEN A3c masks exactly.
# ============================================================

a3c_precheck = []
for row in dev100_df.itertuples(index=False):
    cached_san = io_cache.load_san_scores(
        io_cache.SAN_DEV100_CACHE_DIR / io_cache.san_scores_filename(row.image_id)
    )
    assert cached_san["target_category"] == row.category

    mask_from_cached, thr = semantic.a3c_mask(cached_san["target_score"])
    frozen_mask, frozen_meta = io_cache.load_a3c_mask(
        io_cache.cache_paths(row.dataset_index, row.image_id)["a3c_masks"]
    )
    a3c_precheck.append({
        "dataset_index": row.dataset_index,
        "pixel_mismatch": int((mask_from_cached != frozen_mask).sum()),
        "threshold_diff": abs(thr - frozen_meta["threshold"]),
    })

a3c_precheck_df = pd.DataFrame(a3c_precheck)
n_ok = int((a3c_precheck_df["pixel_mismatch"] == 0).sum())
print(f"A3c from frozen SAN maps == frozen A3c masks : {n_ok}/100 "
      f"{'PASS' if n_ok == 100 else 'FAIL'}")
print(f"Max threshold difference                     : "
      f"{a3c_precheck_df['threshold_diff'].max():.2e}")
assert n_ok == 100, "semantic.a3c_mask does not reproduce ABC — stop."

A3c from frozen SAN maps == frozen A3c masks : 100/100 PASS
Max threshold difference                     : 0.00e+00


In [ ]:
# ============================================================
# Step 3.6 — Build models: SAN, SAM2 AMG, Marigold
# ============================================================

import shutil

# ---- SAN checkpoint: keep one copy on Drive to avoid re-downloads
SAN_URL = semantic.SAN_CHECKPOINT_URL
if not SAN_CHECKPOINT_DRIVE.exists():
    SAN_CHECKPOINT_DRIVE.parent.mkdir(parents=True, exist_ok=True)
    !wget -q -O "{SAN_CHECKPOINT_DRIVE}" "{SAN_URL}"
assert SAN_CHECKPOINT_DRIVE.stat().st_size > 600e6, "SAN checkpoint looks incomplete."

SAN_CHECKPOINT_LOCAL = SAN_ROOT / "output" / "san_vit_b_16.pth"
SAN_CHECKPOINT_LOCAL.parent.mkdir(parents=True, exist_ok=True)
if not SAN_CHECKPOINT_LOCAL.exists():
    shutil.copy2(SAN_CHECKPOINT_DRIVE, SAN_CHECKPOINT_LOCAL)

t0 = time.time()
san_model = semantic.build_san(SAN_ROOT, SAN_CHECKPOINT_LOCAL, device=DEVICE)
print(f"SAN built        : {san_model.__class__.__name__} ({time.time() - t0:.0f} s)")

t0 = time.time()
amg = b0.build_amg(SAM2_CHECKPOINT, device=DEVICE)   # verifies checkpoint SHA256
print(f"SAM2 AMG built   : checkpoint SHA256 verified ({time.time() - t0:.0f} s)")

t0 = time.time()
marigold = depth_mod.build_marigold(device=DEVICE)
print(f"Marigold built   : {depth_mod.MARIGOLD_MODEL_ID} fp16 ({time.time() - t0:.0f} s)")

MODEL_ENV["san_checkpoint_bytes"] = SAN_CHECKPOINT_LOCAL.stat().st_size
MODEL_ENV["sam2_checkpoint_sha256"] = b0.FROZEN_CHECKPOINT_SHA256
print(f"\nGPU memory allocated: {torch.cuda.memory_allocated() / 1e9:.2f} GB")

/usr/local/lib/python3.13/dist-packages/timm/models/layers/__init__.py:49: FutureWarning: Importing from timm.models.layers is deprecated, please import via timm.layers
  warnings.warn(f"Importing from {__name__} is deprecated, please import via timm.layers", FutureWarning)
100%|████████████████████████████████████████| 351M/351M [00:03<00:00, 109MiB/s]
/content/SAN/san/model/side_adapter/timm_wrapper.py:24: UserWarning: Unused kwargs are provided:{'dynamic_img_pad': False, 'device': None, 'dtype': None}.
  warnings.warn(f"Unused kwargs are provided:{kwargs}.")


SAN built        : SAN (15 s)
SAM2 AMG built   : checkpoint SHA256 verified (10 s)


model_index.json:   0%|          | 0.00/534 [00:00<?, ?B/s]

Reconstructing (incomplete total...): |          |  0.00B /  0.00B            

Fetching 12 files:   0%|          | 0/12 [00:00<?, ?it/s]

Loading pipeline components...:   0%|          | 0/5 [00:00<?, ?it/s]

Loading weights:   0%|          | 0/372 [00:00<?, ?it/s]

Marigold built   : prs-eth/marigold-depth-v1-1 fp16 (96 s)

GPU memory allocated: 3.57 GB


In [ ]:
# ============================================================
# Step 3.7 — Regenerate every stage from raw images (dev100)
# ============================================================
#
# For each image: SAN -> A3c, SAM2 AMG -> B0 masks, Marigold -> depth,
# compare each with its frozen cache, then compute SG_v1 and SG_v1.1
# from the FRESH inputs only. Fresh outputs are saved in the frozen
# cache formats (B3R_S3_FRESH) for audit and reuse.
# ============================================================

from tqdm.auto import tqdm

stage_rows = []
timing = {"san": 0.0, "amg": 0.0, "depth": 0.0, "sg": 0.0}
t_all = time.time()

for row in tqdm(dev100_df.itertuples(index=False), total=len(dev100_df)):
    image_path = FSC147_IMAGE_DIR / row.image_id
    frozen = io_cache.cache_paths(row.dataset_index, row.image_id)
    fresh_paths = io_cache.cache_paths(
        row.dataset_index, row.image_id,
        cache_dirs={k: B3R_S3_FRESH / k for k in
                    ["b0_masks", "a3c_masks", "depth", "m1_split_labels"]},
    )

    image_pil = Image.open(image_path).convert("RGB")    # as ABC / M1
    image_rgb = b0.load_image_rgb_cv2(image_path)        # as B2

    # ---- SAN -> A3c
    t = time.time()
    target, background = semantic.run_san(san_model, image_pil, row.category, DEVICE)
    a3c_fresh, a3c_thr = semantic.a3c_mask(target)
    timing["san"] += time.time() - t

    cached_san = io_cache.load_san_scores(
        io_cache.SAN_DEV100_CACHE_DIR / io_cache.san_scores_filename(row.image_id)
    )
    a3c_frozen, _ = io_cache.load_a3c_mask(frozen["a3c_masks"])
    san_absdiff = np.abs(target - cached_san["target_score"])

    # ---- SAM2 AMG -> B0 masks
    t = time.time()
    b0_fresh, b0_meta = b0.run_amg(amg, image_rgb)
    timing["amg"] += time.time() - t
    b0_frozen, _ = io_cache.load_b0_masks(frozen["b0_masks"])
    b0_cmp = b0.compare_mask_sets(b0_fresh, b0_frozen)

    # ---- Marigold -> depth
    t = time.time()
    depth_fresh = depth_mod.run_marigold(marigold, image_pil, DEVICE)
    timing["depth"] += time.time() - t
    depth_frozen = io_cache.load_depth(frozen["depth"])
    depth_absdiff = np.abs(depth_fresh - depth_frozen)

    # ---- SG from FRESH inputs only
    t = time.time()
    s_v1, _ = sg.compute_sg_image(b0_fresh, a3c_fresh, depth_fresh, SG_V1_CFG)
    s_v11, _ = sg.compute_sg_image(b0_fresh, a3c_fresh, depth_fresh, SG_V11_CFG)
    timing["sg"] += time.time() - t

    # ---- Save fresh outputs (frozen formats)
    io_cache.save_san_scores(
        B3R_S3_FRESH / "san" / io_cache.san_scores_filename(row.image_id),
        row.image_id, row.category, target, background,
    )
    io_cache.save_a3c_mask(fresh_paths["a3c_masks"], a3c_fresh, a3c_thr, 90,
                           row.dataset_index, row.image_id, row.category)
    io_cache.save_b0_masks(fresh_paths["b0_masks"], b0_fresh, b0_meta)
    io_cache.save_depth(fresh_paths["depth"], depth_fresh)

    stage_rows.append({
        "dataset_index": row.dataset_index,
        "image_id": row.image_id,
        "category": row.category,
        "density_stratum": row.density_stratum,
        "gt_count": row.gt_count,
        # SAN
        "san_exact": bool(np.array_equal(target, cached_san["target_score"])),
        "san_max_absdiff": float(san_absdiff.max()),
        "san_mean_absdiff": float(san_absdiff.mean()),
        "a3c_pixel_mismatch": int((a3c_fresh != a3c_frozen).sum()),
        # B0
        "b0_count_fresh": b0_cmp["count_a"],
        "b0_count_frozen": b0_cmp["count_b"],
        "b0_exact_mask_set": b0_cmp["exact_multiset_match"],
        "b0_shared_exact": b0_cmp["n_shared_exact"],
        # depth
        "depth_exact": bool(np.array_equal(depth_fresh, depth_frozen)),
        "depth_max_absdiff": float(depth_absdiff.max()),
        # SG from fresh inputs
        "S_count_fresh": s_v1["S_count"],
        "SG_v1_fresh": s_v1["SG_count"],
        "SG_v1_1_fresh": s_v11["SG_count"],
    })

stage_df = pd.DataFrame(stage_rows).sort_values("dataset_index").reset_index(drop=True)
total = time.time() - t_all
print(f"\nImages: {len(stage_df)} | total {total / 60:.1f} min")
for k, v in timing.items():
    print(f"  {k:<6}: {v:7.1f} s  ({v / len(stage_df):.2f} s/image)")

  0%|          | 0/100 [00:00<?, ?it/s]

Marigold predictions...:   0%|          | 0/1 [00:00<?, ?it/s]

Diffusion steps...:   0%|          | 0/4 [00:00<?, ?it/s]

Marigold predictions...:   0%|          | 0/1 [00:00<?, ?it/s]

Diffusion steps...:   0%|          | 0/4 [00:00<?, ?it/s]

...

Marigold predictions...:   0%|          | 0/1 [00:00<?, ?it/s]

Diffusion steps...:   0%|          | 0/4 [00:00<?, ?it/s]

Marigold predictions...:   0%|          | 0/1 [00:00<?, ?it/s]

Diffusion steps...:   0%|          | 0/4 [00:00<?, ?it/s]


Images: 100 | total 11.8 min
  san   :    15.1 s  (0.15 s/image)
  amg   :   453.9 s  (4.54 s/image)
  depth :   110.6 s  (1.11 s/image)
  sg    :    29.7 s  (0.30 s/image)


In [ ]:
# ============================================================
# Step 3.8 — Stage-by-stage verdicts
# ============================================================

cmp3 = stage_df.merge(reference_s3, on="dataset_index", validate="one_to_one")

stage_checks = {
    "SAN map exact":            int(cmp3["san_exact"].sum()),
    "A3c mask identical":       int((cmp3["a3c_pixel_mismatch"] == 0).sum()),
    "B0 count identical":       int((cmp3["b0_count_fresh"] == cmp3["B0_count"]).sum()),
    "B0 mask set identical":    int(cmp3["b0_exact_mask_set"].sum()),
    "Depth bit-exact":          int(cmp3["depth_exact"].sum()),
    "S count identical":        int(np.isclose(cmp3["S_count_fresh"], cmp3["S_count"]).sum()),
    "SG_v1 count identical":    int(np.isclose(cmp3["SG_v1_fresh"], cmp3["SG_count"]).sum()),
    "SG_v1.1 count identical":  int(np.isclose(cmp3["SG_v1_1_fresh"], cmp3["SG_v1_1_count"]).sum()),
}

print("Stage checks (out of 100):")
for k, n in stage_checks.items():
    print(f"  {k:<24}: {n:>3}/100  {'PASS' if n == 100 else 'DIFF'}")

print("\nNumerical differences:")
print(f"  SAN max |diff|   : {cmp3['san_max_absdiff'].max():.3e} "
      f"(mean of per-image means {cmp3['san_mean_absdiff'].mean():.3e})")
print(f"  A3c pixels differing (total)  : {int(cmp3['a3c_pixel_mismatch'].sum())}")
print(f"  Depth max |diff|              : {cmp3['depth_max_absdiff'].max():.3e}")

diff_rows = cmp3[
    (cmp3["a3c_pixel_mismatch"] > 0)
    | ~cmp3["b0_exact_mask_set"]
    | ~cmp3["depth_exact"]
    | ~np.isclose(cmp3["SG_v1_fresh"], cmp3["SG_count"])
]
if len(diff_rows):
    print(f"\nImages with any difference: {len(diff_rows)}")
    display(diff_rows[[
        "dataset_index", "image_id", "density_stratum",
        "san_max_absdiff", "a3c_pixel_mismatch",
        "b0_count_fresh", "B0_count", "b0_exact_mask_set",
        "depth_max_absdiff",
        "S_count_fresh", "S_count", "SG_v1_fresh", "SG_count",
        "SG_v1_1_fresh", "SG_v1_1_count",
    ]])

Stage checks (out of 100):
  SAN map exact           :  61/100  DIFF
  A3c mask identical      :  98/100  DIFF
  B0 count identical      : 100/100  PASS
  B0 mask set identical   : 100/100  PASS
  Depth bit-exact         :   0/100  DIFF
  S count identical       : 100/100  PASS
  SG_v1 count identical   :  96/100  DIFF
  SG_v1.1 count identical :  96/100  DIFF

Numerical differences:
  SAN max |diff|   : 1.144e-05 (mean of per-image means 2.221e-07)
  A3c pixels differing (total)  : 3
  Depth max |diff|              : 4.248e-02

Images with any difference: 100


,dataset_index,image_id,density_stratum,san_max_absdiff,a3c_pixel_mismatch,b0_count_fresh,B0_count,b0_exact_mask_set,depth_max_absdiff,S_count_fresh,S_count,SG_v1_fresh,SG_count,SG_v1_1_fresh,SG_v1_1_count
0,9,215.jpg,S6_95_100,0.000000,0,103,103.0,True,0.003906,108,108,113.0,113.0,113.0,113.0
1,14,220.jpg,S4_60_80,0.000005,0,20,20.0,True,0.006348,52,52,52.0,52.0,52.0,52.0
2,20,228.jpg,S4_60_80,0.000003,0,5,5.0,True,0.008789,27,27,27.0,27.0,27.0,27.0
3,31,241.jpg,S3_40_60,0.000003,0,25,25.0,True,0.005371,27,27,27.0,27.0,27.0,27.0
4,40,252.jpg,S3_40_60,0.000000,0,14,14.0,True,0.004883,15,15,15.0,15.0,15.0,15.0
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
95,1219,7006.jpg,S2_20_40,0.000000,0,12,12.0,True,0.003906,23,23,23.0,23.0,23.0,23.0
96,1256,7013.jpg,S5_80_95,0.000006,0,132,132.0,True,0.005371,138,138,138.0,138.0,138.0,138.0
97,1257,7436.jpg,S6_95_100,0.000000,0,299,299.0,True,0.004883,300,300,300.0,300.0,300.0,300.0
98,1260,7100.jpg,S3_40_60,0.000000,0,40,40.0,True,0.003906,48,48,48.0,48.0,48.0,48.0


In [ ]:
# ============================================================
# Step 3.9 — Save and Section 3 verdict
# ============================================================

from datetime import datetime, timezone

counts_reproduced = (
    stage_checks["S count identical"] == 100
    and stage_checks["SG_v1 count identical"] == 100
    and stage_checks["SG_v1.1 count identical"] == 100
)
inputs_identical = (
    stage_checks["A3c mask identical"] == 100
    and stage_checks["B0 mask set identical"] == 100
    and stage_checks["Depth bit-exact"] == 100
)

if counts_reproduced and inputs_identical:
    verdict = "PASS — all stages and counts reproduced from raw images"
elif counts_reproduced:
    verdict = ("PASS (counts) — SG counts reproduced; minor numerical "
               "differences in intermediate stages (see Step 3.8)")
else:
    verdict = "DIFF — counts not fully reproduced; inspect Step 3.8 before B4"

stage_df.to_csv(B3R_S3_DIR / "B3R_s3_stage_comparison_per_image.csv", index=False)
with open(B3R_S3_DIR / "B3R_s3_metadata.json", "w") as f:
    json.dump({
        "section": "B3R Section 3 — end-to-end reproduction from raw images",
        "date_utc": datetime.now(timezone.utc).isoformat(timespec="seconds"),
        "repo_commit": REPO_COMMIT,
        "model_environment": MODEL_ENV,
        "stage_checks": stage_checks,
        "san_max_absdiff": float(cmp3["san_max_absdiff"].max()),
        "a3c_pixels_differing": int(cmp3["a3c_pixel_mismatch"].sum()),
        "depth_max_absdiff": float(cmp3["depth_max_absdiff"].max()),
        "timing_sec_per_image": {k: v / len(stage_df) for k, v in timing.items()},
        "fresh_cache_dir": str(B3R_S3_FRESH),
        "verdict": verdict,
        "gt_used_for_inference": False,
        "test_set_accessed": False,
    }, f, indent=2, default=str)

print("=" * 80)
print("B3R SECTION 3 — END-TO-END REPRODUCTION")
print("=" * 80)
print("Saved to:", B3R_S3_DIR)
print("\nVERDICT:", verdict)

B3R SECTION 3 — END-TO-END REPRODUCTION
Saved to: /content/drive/MyDrive/MSc_Project_ZeroShot_Counting/results/B3R_SG_Rebuild_and_Fixes/section3_end_to_end

VERDICT: DIFF — counts not fully reproduced; inspect Step 3.8 before B4


In [ ]:
# ============================================================
# Step 3.10 — Diagnostic: which images changed, and how much?
# ============================================================

d = cmp3.merge(
    repro_df[["dataset_index", "stage1_on", "stage2_on", "refinable_components"]],
    on="dataset_index", validate="one_to_one",
)
d["SG_v1_diff"] = d["SG_v1_fresh"] - d["SG_count"]
d["SG_v1_1_diff"] = d["SG_v1_1_fresh"] - d["SG_v1_1_count"]

changed = d[(d["SG_v1_diff"] != 0) | (d["SG_v1_1_diff"] != 0)]
print(f"Images with a different SG count: {len(changed)}")
display(changed[[
    "dataset_index", "image_id", "density_stratum", "gt_count",
    "S_count", "SG_count", "SG_v1_fresh", "SG_v1_diff",
    "SG_v1_1_count", "SG_v1_1_fresh", "SG_v1_1_diff",
    "stage1_on", "stage2_on", "depth_max_absdiff",
]])

def mae(pred):
    return float((pred - d["gt_count"]).abs().mean())

print("\nMAE  frozen-env  ->  current-env")
print(f"  SG_v1   : {mae(d['SG_count']):.2f}  ->  {mae(d['SG_v1_fresh']):.2f}")
print(f"  SG_v1.1 : {mae(d['SG_v1_1_count']):.2f}  ->  {mae(d['SG_v1_1_fresh']):.2f}")
print(f"  S       : {mae(d['S_count']):.2f}  ->  {mae(d['S_count_fresh']):.2f}")

print("\nDepth max |diff| across images:")
print(d["depth_max_absdiff"].describe().round(4))

print("\nAll changed images gate-ON (stage 2)?",
      bool(changed["stage2_on"].all()) if len(changed) else "n/a")

Images with a different SG count: 4


,dataset_index,image_id,density_stratum,gt_count,S_count,SG_count,SG_v1_fresh,SG_v1_diff,SG_v1_1_count,SG_v1_1_fresh,SG_v1_1_diff,stage1_on,stage2_on,depth_max_absdiff
24,183,838.jpg,S5_80_95,113,70,110.0,114.0,4.0,101.0,105.0,4.0,True,True,0.003906
32,253,975.jpg,S6_95_100,718,107,726.0,721.0,-5.0,726.0,721.0,-5.0,True,True,0.015381
93,1192,6969.jpg,S6_95_100,949,53,289.0,290.0,1.0,289.0,290.0,1.0,True,True,0.014038
99,1269,7060.jpg,S4_60_80,65,25,47.0,46.0,-1.0,47.0,46.0,-1.0,True,True,0.017090



MAE  frozen-env  ->  current-env
  SG_v1   : 61.93  ->  61.86
  SG_v1.1 : 61.99  ->  61.90
  S       : 72.00  ->  72.00

Depth max |diff| across images:
count    100.0000
mean       0.0054
std        0.0055
min        0.0010
25%        0.0024
50%        0.0044
75%        0.0063
max        0.0425
Name: depth_max_absdiff, dtype: float64

All changed images gate-ON (stage 2)? True


## Section 3 conclusion — end-to-end reproduction

**Reproduced from raw images (T4, PyTorch 2.11 + CUDA 13.0):**

- B0 AMG masks: identical mask sets on 100/100 images.
- SAN target maps: max |diff| 1.1e-5 (61/100 bit-identical); A3c masks identical on 98/100 (3 pixels differ in total).
- S counts: identical on 100/100.
- Marigold depth: not bit-exact (median max |diff| 0.0044, max 0.0425). Attributed to fp16 kernel differences between CUDA 13.0 (current Colab) and CUDA 12.8 (M1); settings and seed are identical.
- SG_v1 / SG_v1.1 counts: identical on 96/100. The 4 differing images are all Stage-2 gate-ON (838.jpg +4, 975.jpg −5, 6969.jpg +1, 7060.jpg −1). No gate decision changed.
- MAE (frozen env → current env): SG_v1 61.93 → 61.86; SG_v1.1 61.99 → 61.90; S 72.00 → 72.00.

**Finding:** G2 fragment counts are sensitive to small depth perturbations (up to ±5 units from a median depth change of 0.004), including 975.jpg, which carries most of SG's dev100 geometry gain.

**Decision (Option A):** all subsequent stages (held-out caching, B4, GPV, final evaluation) use the current environment consistently, so all compared systems share the same caches. The current-environment dev100 reference is `section3_end_to_end/B3R_s3_stage_comparison_per_image.csv`. The original SG_v1 / SG_v1.1 figures remain the development record.

# 4. SG_v1.1 — Fragment-level double-counting fix

## Problem

In SG_v1, a refinable C1 recovery component adds all its retained G2 fragments as extra units. Only the component **centroid** is tested against B0 masks. Retained fragments lying **inside** B0 masks represent objects B0 has already counted, so they are counted twice.

## Fix (no new parameters)

Apply the existing C1 coverage rule (np.rint + clip → mask pixel) to each **retained G2 fragment centroid**:

    extra_v1.1 = max(number of uncovered retained fragments − 1, 0)

(−1 because the component's own +1 is already in S.)

**The gate is unchanged:** Stage-1 and Stage-2 decisions are computed on the SG_v1 extra units, so only the counted units differ.

## Pre-declared decision rule (written before seeing results)

- SG_v1.1 is adopted as the **primary candidate for B4** because it removes a logical double count. This holds **regardless of its dev100 effect**, including if it changes few or no images.
- It is rejected only if the consistency checks fail (gates, S or B0 differ from SG_v1).
- SG_v1 is reported alongside SG_v1.1 in B4.
- No dev100 tuning.

In [ ]:
# ============================================================
# Step 4.1 — Load Section 2 SG_v1 results and build v1.1 config
# ============================================================
#
# Requires Section 1 (paths, modules, config) to have been run.
# ============================================================

import copy
import json

import numpy as np
import pandas as pd

B3R_S4_DIR = B3R_DIR / "section4_SG_v1_1"
B3R_S4_DIR.mkdir(parents=True, exist_ok=True)

# SG_v1 results produced by the rebuilt code in Section 2
with open(B3R_S2_DIR / "B3R_s2_metadata.json") as f:
    s2_meta = json.load(f)
assert s2_meta["all_pass"], "Section 2 did not pass — do not proceed."

v1_df = (
    pd.read_csv(B3R_S2_DIR / "B3R_s2_SG_v1_per_image.csv")
    .sort_values("dataset_index")
    .reset_index(drop=True)
)
assert len(v1_df) == 100

SG_V11_CFG = sg.SGConfig.from_frozen_json(SG_V1_CONFIG_FILE, variant="v1.1")

# Configs must differ ONLY in the variant flag
v1_cfg_dict = SG_V1_CFG.to_dict()
v11_cfg_dict = SG_V11_CFG.to_dict()
cfg_diff = {
    k: (v1_cfg_dict[k], v11_cfg_dict[k])
    for k in v1_cfg_dict
    if v1_cfg_dict[k] != v11_cfg_dict[k]
}
assert cfg_diff == {"variant": ("v1", "v1.1")}, cfg_diff

print("Section 2 SG_v1 results loaded :", len(v1_df), "images")
print("Config difference v1 → v1.1    :", cfg_diff)
print("Output folder                  :", B3R_S4_DIR)

Section 2 SG_v1 results loaded : 100 images
Config difference v1 → v1.1    : {'variant': ('v1', 'v1.1')}
Output folder                  : /content/drive/MyDrive/MSc_Project_ZeroShot_Counting/results/B3R_SG_Rebuild_and_Fixes/section4_SG_v1_1


In [ ]:
# ============================================================
# Step 4.2 — Compute SG_v1.1 on dev100 + consistency checks
# ============================================================

import time
from tqdm.auto import tqdm

v11_rows = []
v11_component_rows = []
t0 = time.time()

for row in tqdm(dev100_df.itertuples(index=False), total=len(dev100_df)):
    paths = io_cache.cache_paths(row.dataset_index, row.image_id)

    b0_masks, _ = io_cache.load_b0_masks(paths["b0_masks"])
    a3c_mask, _ = io_cache.load_a3c_mask(paths["a3c_masks"])
    depth = io_cache.load_depth(paths["depth"])

    summary, components = sg.compute_sg_image(
        b0_masks, a3c_mask, depth, SG_V11_CFG
    )

    v11_rows.append({
        "dataset_index": row.dataset_index,
        "image_id": row.image_id,
        "category": row.category,
        "density_stratum": row.density_stratum,
        "gt_count": row.gt_count,
        **summary,
    })
    for comp in components:
        v11_component_rows.append({"dataset_index": row.dataset_index, **comp})

v11_df = pd.DataFrame(v11_rows).sort_values("dataset_index").reset_index(drop=True)
v11_components_df = pd.DataFrame(v11_component_rows)

print(f"Runtime: {time.time() - t0:.1f} s")

# ------------------------------------------------------------
# Consistency: everything except the counted G units must be
# identical to SG_v1.
# ------------------------------------------------------------

both = v1_df.merge(
    v11_df,
    on=["dataset_index", "image_id", "category", "density_stratum", "gt_count"],
    suffixes=("_v1", "_v11"),
    validate="one_to_one",
)
assert len(both) == 100

MUST_MATCH = [
    "B0_count",
    "C1_components",
    "C1_recovery",
    "S_count",
    "split_candidates",
    "candidate_area_fraction",
    "stage1_on",
    "refinable_components",
    "G2_extra_refinable_v1",
    "stage2_feature",
    "stage2_on",
]

consistency = {}
print("\nConsistency with SG_v1 (out of 100):")
for col in MUST_MATCH:
    a, b = both[f"{col}_v1"], both[f"{col}_v11"]
    ok = np.isclose(a.astype(float), b.astype(float), rtol=0, atol=1e-12)
    consistency[col] = int(ok.sum())
    print(f"  {col:<26}: {int(ok.sum())}/100  {'PASS' if ok.all() else 'FAIL'}")

# v1.1 count must equal its closed-form definition
derived_v11 = both["S_count_v11"] + np.where(
    both["stage2_on_v11"],
    SG_V11_CFG.correction_weight * both["G2_extra_refinable_v11_v11"],
    0.0,
)
formula_ok = np.allclose(both["SG_count_v11"], derived_v11, rtol=0, atol=1e-12)
consistency["v1.1 formula"] = 100 if formula_ok else 0
print(f"  {'SG_v1.1 = S + gated v1.1 units':<26}: {'PASS' if formula_ok else 'FAIL'}")

CONSISTENCY_PASS = all(v == 100 for v in consistency.values())
print("\nConsistency:", "PASS" if CONSISTENCY_PASS else "FAIL")

  0%|          | 0/100 [00:00<?, ?it/s]

Runtime: 16.8 s

Consistency with SG_v1 (out of 100):
  B0_count                  : 100/100  PASS
  C1_components             : 100/100  PASS
  C1_recovery               : 100/100  PASS
  S_count                   : 100/100  PASS
  split_candidates          : 100/100  PASS
  candidate_area_fraction   : 100/100  PASS
  stage1_on                 : 100/100  PASS
  refinable_components      : 100/100  PASS
  G2_extra_refinable_v1     : 100/100  PASS
  stage2_feature            : 100/100  PASS
  stage2_on                 : 100/100  PASS
  SG_v1.1 = S + gated v1.1 units: PASS

Consistency: PASS


In [ ]:
# ============================================================
# Step 4.3 — What did the fix change?
# ============================================================

chg = both[[
    "dataset_index", "image_id", "category", "density_stratum", "gt_count",
    "S_count_v1", "stage2_on_v1",
    "G_effective_v1", "G_effective_v11",
    "SG_count_v1", "SG_count_v11",
]].rename(columns={
    "S_count_v1": "S_count",
    "stage2_on_v1": "gate_on",
    "SG_count_v1": "SG_v1",
    "SG_count_v11": "SG_v1_1",
})

chg["units_removed"] = chg["G_effective_v1"] - chg["G_effective_v11"]
assert (chg["units_removed"] >= 0).all(), "v1.1 must never add units."

chg["err_v1"] = chg["SG_v1"] - chg["gt_count"]
chg["err_v1_1"] = chg["SG_v1_1"] - chg["gt_count"]
chg["abs_change"] = chg["err_v1_1"].abs() - chg["err_v1"].abs()

affected = chg[chg["units_removed"] > 0]

print("IMAGE LEVEL")
print(f"  Gate-ON images               : {int(chg['gate_on'].sum())}")
print(f"  Images changed by v1.1       : {len(affected)}")
print(f"  Geometry units (SG_v1)       : {int(chg['G_effective_v1'].sum())}")
print(f"  Geometry units (SG_v1.1)     : {int(chg['G_effective_v11'].sum())}")
print(f"  Units removed (double count) : {int(chg['units_removed'].sum())}")

# ---- Component level (refinable components in gate-ON images)
gate_on_ids = set(chg.loc[chg["gate_on"], "dataset_index"])
gated_comps = v11_components_df[
    v11_components_df["refinable"]
    & v11_components_df["dataset_index"].isin(gate_on_ids)
].copy()
gated_comps["covered_retained"] = gated_comps["G2_count"] - gated_comps["uncovered_retained"]

print("\nCOMPONENT LEVEL (refinable components in gate-ON images)")
print(f"  Components                   : {len(gated_comps)}")
print(f"  Components changed           : {int((gated_comps['extra_v11'] < gated_comps['extra_v1']).sum())}")
print(f"  Retained G2 fragments        : {int(gated_comps['G2_count'].sum())}")
print(f"  ...covered by B0 masks       : {int(gated_comps['covered_retained'].sum())} "
      f"({gated_comps['covered_retained'].sum() / max(gated_comps['G2_count'].sum(), 1):.1%})")

# ---- By stratum
STRATA = ["S1_0_20", "S2_20_40", "S3_40_60", "S4_60_80", "S5_80_95", "S6_95_100"]
by_stratum_chg = (
    chg.groupby("density_stratum")
    .agg(
        images=("dataset_index", "size"),
        gate_on=("gate_on", "sum"),
        changed=("units_removed", lambda s: int((s > 0).sum())),
        units_removed=("units_removed", "sum"),
    )
    .reindex(STRATA)
)
print("\nBy density stratum:")
display(by_stratum_chg)

# ---- Affected images (GT used for evaluation only)
if len(affected):
    print("\nChanged images (sorted by units removed):")
    display(
        affected.sort_values("units_removed", ascending=False)[[
            "dataset_index", "image_id", "category", "density_stratum",
            "gt_count", "S_count", "SG_v1", "SG_v1_1", "units_removed",
            "err_v1", "err_v1_1", "abs_change",
        ]]
    )
    print(f"Improved (|error| decreased) : {int((affected['abs_change'] < 0).sum())}")
    print(f"Worsened (|error| increased) : {int((affected['abs_change'] > 0).sum())}")
    print(f"Unchanged |error|            : {int((affected['abs_change'] == 0).sum())}")
else:
    print("\nSG_v1.1 changes no dev100 image.")

IMAGE LEVEL
  Gate-ON images               : 16
  Images changed by v1.1       : 6
  Geometry units (SG_v1)       : 1205
  Geometry units (SG_v1.1)     : 1169
  Units removed (double count) : 36

COMPONENT LEVEL (refinable components in gate-ON images)
  Components                   : 98
  Components changed           : 9
  Retained G2 fragments        : 1303
  ...covered by B0 masks       : 36 (2.8%)

By density stratum:


,images,gate_on,changed,units_removed
density_stratum,,,,
S1_0_20,20,3,2,5.0
S2_20_40,20,2,0,0.0
S3_40_60,20,3,1,2.0
S4_60_80,20,3,2,20.0
S5_80_95,10,1,1,9.0
S6_95_100,10,4,0,0.0



Changed images (sorted by units removed):


,dataset_index,image_id,category,density_stratum,gt_count,S_count,SG_v1,SG_v1_1,units_removed,err_v1,err_v1_1,abs_change
83,1061,6286.jpg,pills,S4_60_80,49,5,25.0,13.0,12.0,-24.0,-36.0,12.0
24,183,838.jpg,books,S5_80_95,113,70,110.0,101.0,9.0,-3.0,-12.0,9.0
78,968,5896.jpg,grapes,S4_60_80,55,44,73.0,65.0,8.0,18.0,10.0,-8.0
19,170,824.jpg,bottle caps,S1_0_20,9,18,25.0,22.0,3.0,16.0,13.0,-3.0
13,119,737.jpg,ants,S1_0_20,9,13,19.0,17.0,2.0,10.0,8.0,-2.0
69,845,5101.jpg,chicken wings,S3_40_60,23,30,40.0,38.0,2.0,17.0,15.0,-2.0


Improved (|error| decreased) : 4
Worsened (|error| increased) : 2
Unchanged |error|            : 0


In [ ]:
# ============================================================
# Step 4.4 — Metrics: B0, S, SG_v1, SG_v1.1 (+ paired bootstrap)
# ============================================================
#
# Caveat: dev100 was used to develop SG, so these numbers are
# optimistic. They describe the fix; B4 tests it.
# ============================================================

def count_metrics(pred, gt):
    err = np.asarray(pred, float) - np.asarray(gt, float)
    return {
        "MAE": float(np.abs(err).mean()),
        "RMSE": float(np.sqrt((err ** 2).mean())),
        "mean_signed_error": float(err.mean()),
    }

SYSTEMS = {
    "B0": both["B0_count_v1"],
    "S": chg["S_count"],
    "SG_v1": chg["SG_v1"],
    "SG_v1.1": chg["SG_v1_1"],
}
gt = chg["gt_count"]

# ---- Overall and S1-S5 / S6
subsets = {
    "all (100)": np.ones(len(chg), bool),
    "S1-S5 (90)": (chg["density_stratum"] != "S6_95_100").to_numpy(),
    "S6 (10)": (chg["density_stratum"] == "S6_95_100").to_numpy(),
}
rows = []
for subset, m in subsets.items():
    for name, pred in SYSTEMS.items():
        rows.append({"subset": subset, "system": name,
                     **count_metrics(pred[m], gt[m])})
metrics_s4_df = pd.DataFrame(rows)
display(
    metrics_s4_df.pivot(index="system", columns="subset", values="MAE")
    .reindex(list(SYSTEMS))
    .round(2)
)

# ---- MAE by stratum
mae_by_stratum = pd.DataFrame({
    name: (pred - gt).abs().groupby(chg["density_stratum"]).mean()
    for name, pred in SYSTEMS.items()
}).reindex(STRATA)
print("\nMAE by density stratum:")
display(mae_by_stratum.round(2))

# ---- Paired bootstrap of MAE difference
def paired_bootstrap_mae_diff(pred_a, pred_b, gt, n_boot=10000, seed=0):
    # Returns observed MAE(b) - MAE(a), 95% CI, P(diff < 0)
    ea = np.abs(np.asarray(pred_a, float) - np.asarray(gt, float))
    eb = np.abs(np.asarray(pred_b, float) - np.asarray(gt, float))
    rng = np.random.default_rng(seed)
    idx = rng.integers(0, len(ea), size=(n_boot, len(ea)))
    diffs = (eb[idx] - ea[idx]).mean(axis=1)
    return {
        "observed_diff": float(eb.mean() - ea.mean()),
        "ci_low": float(np.percentile(diffs, 2.5)),
        "ci_high": float(np.percentile(diffs, 97.5)),
        "p_improvement": float((diffs < 0).mean()),
    }

boot_rows = []
for a, b in [("SG_v1", "SG_v1.1"), ("S", "SG_v1.1"), ("S", "SG_v1")]:
    boot_rows.append({
        "comparison": f"{b} vs {a}",
        **paired_bootstrap_mae_diff(SYSTEMS[a], SYSTEMS[b], gt),
    })
bootstrap_s4_df = pd.DataFrame(boot_rows)
print("\nPaired bootstrap (MAE difference; negative = second system better):")
display(bootstrap_s4_df.round(3))

subset,S1-S5 (90),S6 (10),all (100)
system,,,
B0,20.44,622.9,80.69
S,14.57,588.9,72.00
SG_v1,14.26,491.0,61.93
SG_v1.1,14.32,491.0,61.99



MAE by density stratum:


,B0,S,SG_v1,SG_v1.1
density_stratum,,,,
S1_0_20,5.15,4.55,5.95,5.7
S2_20_40,6.55,5.60,6.80,6.8
S3_40_60,14.95,8.95,8.70,8.6
S4_60_80,34.30,24.15,22.40,22.6
S5_80_95,62.10,44.60,40.60,41.5
S6_95_100,622.90,588.90,491.00,491.0



Paired bootstrap (MAE difference; negative = second system better):


,comparison,observed_diff,ci_low,ci_high,p_improvement
0,SG_v1.1 vs SG_v1,0.06,-0.27,0.43,0.378
1,SG_v1.1 vs S,-10.01,-24.83,-0.40,0.990
2,SG_v1 vs S,-10.07,-24.89,-0.49,0.989


In [ ]:
# ============================================================
# Step 4.5 — Freeze SG_v1.1 and save artefacts
# ============================================================

from datetime import datetime, timezone

assert CONSISTENCY_PASS, "Consistency checks failed — SG_v1.1 must not be frozen."

def mae_of(system, subset="all (100)"):
    m = metrics_s4_df
    return float(m.loc[(m["system"] == system) & (m["subset"] == subset), "MAE"].iloc[0])

def rmse_of(system, subset="all (100)"):
    m = metrics_s4_df
    return float(m.loc[(m["system"] == system) & (m["subset"] == subset), "RMSE"].iloc[0])

# ---- Frozen config: SG_v1 + the single documented change
v11_config = copy.deepcopy(sg_v1_config_raw)
v11_config.pop("erratum", None)

v11_config.update({
    "architecture_id": "SG_v1.1",
    "architecture_formula": "B0 + C1 + adaptive G2 (B0-deduplicated fragments)",
    "status": "FROZEN_FOR_HELDOUT_FSC147_VALIDATION",
    "parent_architecture": "SG_v1",
    "parent_erratum_applied": True,
    "change_from_parent": {
        "type": "correctness fix (fragment-level double counting)",
        "rule": (
            "A refinable component's extra units count only retained G2 "
            "fragments whose rounded, clipped centroid lies outside every "
            "B0 mask: extra = max(n_uncovered_retained - 1, 0)."
        ),
        "gate_unchanged": (
            "Stage-1 and Stage-2 decisions are computed on SG_v1 extra units."
        ),
        "new_parameters": None,
        "decision_rule": (
            "Pre-declared: adopt as primary for B4 regardless of dev100 "
            "effect, unless consistency checks fail."
        ),
    },
    "implementation": {
        "module": "src/pipeline/sg.py",
        "function": "compute_sg_image",
        "variant_flag": "v1.1",
        "repo_commit": REPO_COMMIT,
        "library_versions": LIB_VERSIONS,
    },
    "development_reference_metrics": {
        "B0_MAE": mae_of("B0"),
        "S_MAE": mae_of("S"),
        "SG_v1_MAE": mae_of("SG_v1"),
        "SG_v1_RMSE": rmse_of("SG_v1"),
        "SG_v1_1_MAE": mae_of("SG_v1.1"),
        "SG_v1_1_RMSE": rmse_of("SG_v1.1"),
        "SG_v1_1_MAE_S1_S5": mae_of("SG_v1.1", "S1-S5 (90)"),
        "images_changed_vs_SG_v1": int(len(affected)),
        "units_removed_vs_SG_v1": int(chg["units_removed"].sum()),
    },
    "validation_policy": {
        "next_stage": "B4 — remaining FSC-147 validation images not in dev100",
        "parameters_may_be_retuned_before_validation": False,
        "primary_architecture": "SG_v1.1",
        "also_reported": ["SG_v1", "S"],
        "optional_variant_to_evaluate": "SDG",
        "FSC147_test_set_reserved": True,
        "test_set_accessed": False,
    },
})
v11_config["geometry"]["counted_units_rule"] = "B0-deduplicated retained fragments (v1.1)"

V11_CONFIG_FILE = B3R_DIR / "SG_v1.1_frozen_config.json"
with open(V11_CONFIG_FILE, "w") as f:
    json.dump(v11_config, f, indent=2)

# ---- Tables
v11_df.to_csv(B3R_S4_DIR / "B3R_s4_SG_v1_1_per_image.csv", index=False)
v11_components_df.to_csv(B3R_S4_DIR / "B3R_s4_SG_v1_1_components.csv", index=False)
chg.to_csv(B3R_S4_DIR / "B3R_s4_change_vs_SG_v1.csv", index=False)
metrics_s4_df.to_csv(B3R_S4_DIR / "B3R_s4_metrics.csv", index=False)
mae_by_stratum.to_csv(B3R_S4_DIR / "B3R_s4_mae_by_stratum.csv")
bootstrap_s4_df.to_csv(B3R_S4_DIR / "B3R_s4_bootstrap.csv", index=False)

with open(B3R_S4_DIR / "B3R_s4_metadata.json", "w") as f:
    json.dump({
        "section": "B3R Section 4 — SG_v1.1 double-counting fix",
        "date_utc": datetime.now(timezone.utc).isoformat(timespec="seconds"),
        "repo_commit": REPO_COMMIT,
        "consistency": consistency,
        "consistency_pass": bool(CONSISTENCY_PASS),
        "images_changed": int(len(affected)),
        "units_removed": int(chg["units_removed"].sum()),
        "frozen_config": str(V11_CONFIG_FILE),
        "gt_used_for_inference": False,
        "test_set_accessed": False,
    }, f, indent=2)

print("=" * 80)
print("B3R SECTION 4 — SG_v1.1 FROZEN")
print("=" * 80)
print(f"Images changed vs SG_v1 : {len(affected)}")
print(f"Units removed           : {int(chg['units_removed'].sum())}")
print(f"SG_v1   MAE / RMSE      : {mae_of('SG_v1'):.2f} / {rmse_of('SG_v1'):.2f}")
print(f"SG_v1.1 MAE / RMSE      : {mae_of('SG_v1.1'):.2f} / {rmse_of('SG_v1.1'):.2f}")
print(f"\nFrozen config           : {V11_CONFIG_FILE}")
print(f"Tables                  : {B3R_S4_DIR}")
print("\nVERDICT: PASS — SG_v1.1 frozen as primary B4 candidate (SG_v1 reported alongside)")

B3R SECTION 4 — SG_v1.1 FROZEN
Images changed vs SG_v1 : 6
Units removed           : 36
SG_v1   MAE / RMSE      : 61.93 / 246.59
SG_v1.1 MAE / RMSE      : 61.99 / 246.59

Frozen config           : /content/drive/MyDrive/MSc_Project_ZeroShot_Counting/results/B3R_SG_Rebuild_and_Fixes/SG_v1.1_frozen_config.json
Tables                  : /content/drive/MyDrive/MSc_Project_ZeroShot_Counting/results/B3R_SG_Rebuild_and_Fixes/section4_SG_v1_1

VERDICT: PASS — SG_v1.1 frozen as primary B4 candidate (SG_v1 reported alongside)


# 5. Dataset and metric fixes (CPU)

## Purpose

Prepare the dataset loaders and evaluation code for the multi-label stage (OmniCount-191) and record dataset facts that affect the evaluation protocol. **No models run here.**

## Changes in the repo (commit before running Section 1)

**`src/datasets.py`**
- OmniCount: GT `points` = box centres (previously empty).
- Each OmniCount sample carries `domain_vocabulary` (classes to query) and `prompt_names` (text prompts). GT class keys are never changed.
- Roboflow placeholder classes (`autonomousvehicle`, `lands`, `Fruits`) excluded from the vocabulary.

**`src/evaluation.py`**
- Single-label: adds NAE.
- Multi-label, two protocols:
  1. **Standard** (Chattopadhyay et al. 2017): every image queried for its whole domain vocabulary; mRMSE = mean of per-class RMSE; mRMSE-nz over images where the class is present.
  2. **OmniCount reference code**: exact port of OmniCount's released `metrics/metric_multi.py`, needed only to compare with numbers in the OmniCount paper. It evaluates only GT-present classes and divides the summed per-class RMSE by the number of **images**.

## Steps

| Step | Content |
|---|---|
| 5.1 | Setup and module reload |
| 5.2 | OmniCount split / class audit (placeholders, duplicates, test size vs paper) |
| 5.3 | Split-overlap audit (val vs test leakage) |
| 5.4 | Loader checks (points, vocabularies, prompt names) |
| 5.5 | Metric checks (hand-computed cases, FSC regression, protocol comparison on val GT) |
| 5.6 | Save and verdict |

**FSC-147 test and OmniCount-191 test predictions are not used.** Test GT is read only for counts and overlap checks.

In [5]:
# ============================================================
# Step 5.1 — Setup and module reload
# ============================================================

import hashlib
import importlib
import json
import re
from collections import Counter, defaultdict
from datetime import datetime, timezone

import numpy as np
import pandas as pd

import src.datasets as datasets_mod
import src.evaluation as evaluation_mod
importlib.reload(datasets_mod)
importlib.reload(evaluation_mod)

assert hasattr(datasets_mod, "omnicount_prompt_name"), (
    "Old src/datasets.py loaded — commit the Section-5 version and re-run Section 1."
)
assert hasattr(evaluation_mod, "evaluate_multi_label_counts"), (
    "Old src/evaluation.py loaded — commit the Section-5 version and re-run Section 1."
)

OMNICOUNT_ROOT = PROJECT_ROOT / "datasets" / "OmniCount-191"
assert OMNICOUNT_ROOT.exists(), OMNICOUNT_ROOT

B3R_S5_DIR = B3R_DIR / "section5_dataset_metric_fixes"
B3R_S5_DIR.mkdir(parents=True, exist_ok=True)

DOMAINS = datasets_mod.OMNICOUNT_DOMAINS
DISK_SPLITS = {"train": "train", "val": "valid", "test": "test"}
PAPER_TEST_IMAGES = 3252   # OmniCount paper, "Datasets" paragraph

print("Repo commit    :", REPO_COMMIT)
print("OmniCount root :", OMNICOUNT_ROOT)
print("Output         :", B3R_S5_DIR)

Repo commit    : 785d0b59c8bff918d9dc8861b4a5cb6113045e8e
OmniCount root : /content/drive/MyDrive/MSc_Project_ZeroShot_Counting/datasets/OmniCount-191
Output         : /content/drive/MyDrive/MSc_Project_ZeroShot_Counting/results/B3R_SG_Rebuild_and_Fixes/section5_dataset_metric_fixes


In [6]:
# ============================================================
# Step 5.2 — OmniCount split / class audit (raw COCO files)
# ============================================================

def load_coco(domain, split):
    path = OMNICOUNT_ROOT / domain / DISK_SPLITS[split] / "_annotations.coco.json"
    if not path.exists():
        return None
    with open(path) as f:
        return json.load(f)

split_rows, class_rows, issue_rows = [], [], []
COCO = {}

for domain in DOMAINS:
    for split in ["train", "val", "test"]:
        coco = load_coco(domain, split)
        COCO[(domain, split)] = coco
        if coco is None:
            split_rows.append({"domain": domain, "split": split, "present": False,
                               "images": 0, "annotations": 0, "categories": 0})
            continue

        id_to_name = {c["id"]: c["name"] for c in coco["categories"]}
        ann_per_cat = Counter(a["category_id"] for a in coco["annotations"])

        name_counts = Counter(id_to_name.values())
        for name, k in name_counts.items():
            if k > 1:
                issue_rows.append({"domain": domain, "split": split,
                                   "issue": "duplicate category name",
                                   "detail": f"'{name}' used by {k} ids"})
        for cid, name in id_to_name.items():
            if name in datasets_mod.OMNICOUNT_PLACEHOLDER_CLASSES and ann_per_cat.get(cid, 0) > 0:
                issue_rows.append({"domain": domain, "split": split,
                                   "issue": "placeholder class has annotations",
                                   "detail": f"'{name}': {ann_per_cat[cid]} boxes"})
            if split != "train":
                class_rows.append({"domain": domain, "split": split, "class": name,
                                   "category_id": cid,
                                   "boxes": ann_per_cat.get(cid, 0),
                                   "placeholder": name in datasets_mod.OMNICOUNT_PLACEHOLDER_CLASSES})

        split_rows.append({"domain": domain, "split": split, "present": True,
                           "images": len(coco["images"]),
                           "annotations": len(coco["annotations"]),
                           "categories": len(coco["categories"])})

split_df = pd.DataFrame(split_rows)
class_df = pd.DataFrame(class_rows)
issues_df = pd.DataFrame(issue_rows, columns=["domain", "split", "issue", "detail"])

print("Images per domain and split:")
display(split_df.pivot(index="domain", columns="split", values="images")
        .reindex(columns=["train", "val", "test"]).fillna(0).astype(int))

test_total = int(split_df.loc[split_df["split"] == "test", "images"].sum())
val_total = int(split_df.loc[split_df["split"] == "val", "images"].sum())
print(f"\nTest images (download) : {test_total}")
print(f"Test images (paper)    : {PAPER_TEST_IMAGES}")
print(f"Val images (download)  : {val_total}")
print("Domains without test   :", list(split_df.query("split == 'test' and not present")["domain"]))

test_classes = class_df[(class_df["split"] == "test") & ~class_df["placeholder"]]
zero_box_test = test_classes[test_classes["boxes"] == 0]
print(f"\nNon-placeholder classes with 0 test boxes: {len(zero_box_test)} "
      f"(of {len(test_classes)})")

print("\nIssues found:")
display(issues_df if len(issues_df) else pd.DataFrame([{"issue": "none"}]))

Images per domain and split:


split,train,val,test
domain,,,
Birds,25,5,10
Fruits,2424,303,303
Household,361,0,0
Pets,33,15,11
Satellite,2607,254,127
Supermarket,5250,492,251
Urban,7000,2000,1000
Vegetables,329,2,0
Wild,6675,507,255



Test images (download) : 1957
Test images (paper)    : 3252
Val images (download)  : 3578
Domains without test   : ['Household', 'Vegetables']

Non-placeholder classes with 0 test boxes: 23 (of 121)

Issues found:


,domain,split,issue,detail
0,Supermarket,train,duplicate category name,'planet-oat-original' used by 2 ids
1,Supermarket,val,duplicate category name,'planet-oat-original' used by 2 ids
2,Supermarket,test,duplicate category name,'planet-oat-original' used by 2 ids


In [7]:
# ============================================================
# Step 5.3 — Split-overlap audit (val vs test leakage)
# ============================================================
#
# Roboflow file names look like  <source>_jpg.rf.<hash>.jpg
#   exact name  : same exported file
#   source stem : same original image (possibly a different augmentation)
# For any domain with exact-name overlap, file contents are hashed too.
# ============================================================

def source_stem(file_name):
    return re.split(r"\.rf\.", file_name)[0]

def md5_of(path, block=1 << 20):
    h = hashlib.md5()
    with open(path, "rb") as f:
        for chunk in iter(lambda: f.read(block), b""):
            h.update(chunk)
    return h.hexdigest()

overlap_rows = []
for domain in DOMAINS:
    names = {s: {im["file_name"] for im in COCO[(domain, s)]["images"]}
             for s in ["train", "val", "test"] if COCO[(domain, s)] is not None}
    for a, b in [("val", "test"), ("train", "test"), ("train", "val")]:
        if a not in names or b not in names:
            continue
        exact = names[a] & names[b]
        stems = {source_stem(n) for n in names[a]} & {source_stem(n) for n in names[b]}
        overlap_rows.append({"domain": domain, "pair": f"{a}-{b}",
                             f"n_{a}": len(names[a]), f"n_{b}": len(names[b]),
                             "exact_name_overlap": len(exact),
                             "source_stem_overlap": len(stems)})

overlap_df = pd.DataFrame(overlap_rows)
display(overlap_df[["domain", "pair", "exact_name_overlap", "source_stem_overlap"]])

# Content check for val-test pairs with exact-name overlap
content_rows = []
for r in overlap_df.query("pair == 'val-test' and exact_name_overlap > 0").itertuples():
    shared = sorted({im["file_name"] for im in COCO[(r.domain, "val")]["images"]}
                    & {im["file_name"] for im in COCO[(r.domain, "test")]["images"]})
    identical = sum(
        md5_of(OMNICOUNT_ROOT / r.domain / "valid" / n) ==
        md5_of(OMNICOUNT_ROOT / r.domain / "test" / n)
        for n in shared
    )
    content_rows.append({"domain": r.domain, "shared_names": len(shared),
                         "byte_identical": identical})
content_df = pd.DataFrame(content_rows, columns=["domain", "shared_names", "byte_identical"])
print("\nVal-test shared files, content check:")
display(content_df if len(content_df) else pd.DataFrame([{"result": "no exact-name overlap"}]))

LEAKY_VAL_DOMAINS = sorted(
    set(overlap_df.query("pair == 'val-test' and (exact_name_overlap > 0 or source_stem_overlap > 0)")["domain"])
)
print("\nDomains whose val split overlaps test (exclude from multi-label development):",
      LEAKY_VAL_DOMAINS or "none")

,domain,pair,exact_name_overlap,source_stem_overlap
0,Birds,val-test,0,0
1,Birds,train-test,0,0
2,Birds,train-val,0,0
3,Fruits,val-test,0,45
4,Fruits,train-test,0,223
5,Fruits,train-val,0,230
6,Pets,val-test,0,0
7,Pets,train-test,0,0
8,Pets,train-val,0,0
9,Satellite,val-test,0,0



Val-test shared files, content check:


,result
0,no exact-name overlap



Domains whose val split overlaps test (exclude from multi-label development): ['Fruits', 'Supermarket', 'Wild']


In [8]:
# ============================================================
# Step 5.4 — Loader checks: points, vocabularies, prompt names
# ============================================================

loader_rows = []
vocab_rows = []
for split in ["val", "test"]:
    ds = datasets_mod.OmniCount191Dataset(OMNICOUNT_ROOT, split=split, load_images=False)
    bad_points = bad_centres = not_in_vocab = 0
    for i in range(len(ds)):
        s = ds[i]
        for c, v in s["categories"].items():
            if len(v["points"]) != len(v["boxes"]) or v["count"] != len(v["boxes"]):
                bad_points += 1
            for (px, py) in v["points"]:
                if not (0 <= px <= s["width"] and 0 <= py <= s["height"]):
                    bad_centres += 1
            if c not in s["domain_vocabulary"]:
                not_in_vocab += 1
    loader_rows.append({"split": split, "images": len(ds),
                        "points!=boxes (class entries)": bad_points,
                        "centres outside image": bad_centres,
                        "GT classes outside vocabulary": not_in_vocab})
    for domain, vocab in ds.domain_vocabulary.items():
        vocab_rows.append({"split": split, "domain": domain, "vocabulary_size": len(vocab)})

loader_df = pd.DataFrame(loader_rows)
display(loader_df)
LOADER_PASS = bool((loader_df.iloc[:, 2:] == 0).all().all())
print("Loader checks:", "PASS" if LOADER_PASS else "FAIL")

vocab_df = pd.DataFrame(vocab_rows)
print("\nQuery vocabulary size per domain:")
display(vocab_df.pivot(index="domain", columns="split", values="vocabulary_size"))

# Prompt names that differ from the raw annotation name (for review)
all_classes = sorted({c for (d, s), coco in COCO.items()
                      if coco is not None and s != "train"
                      for c in [x["name"] for x in coco["categories"]]}
                     - datasets_mod.OMNICOUNT_PLACEHOLDER_CLASSES)
prompt_df = pd.DataFrame([
    {"class": c, "prompt": datasets_mod.omnicount_prompt_name(c),
     "explicit_mapping": c in datasets_mod.OMNICOUNT_PROMPT_NAMES}
    for c in all_classes
])
changed = prompt_df[prompt_df["explicit_mapping"]]
print(f"\nExplicit prompt mappings ({len(changed)}) — please review:")
display(changed)

,split,images,points!=boxes (class entries),centres outside image,GT classes outside vocabulary
0,val,3578,0,0,0
1,test,1957,0,0,0


Loader checks: PASS

Query vocabulary size per domain:


split,test,val
domain,,
Birds,3.0,3.0
Fruits,8.0,8.0
Pets,18.0,18.0
Satellite,23.0,23.0
Supermarket,52.0,52.0
Urban,12.0,12.0
Vegetables,NaN,13.0
Wild,4.0,4.0



Explicit prompt mappings (14) — please review:


,class,prompt,explicit_mapping
16,Cerealbox,cereal box,True
32,Galia,galia melon,True
48,Orange green,green orange,True
49,Orange ripe,ripe orange,True
79,bike,bicycle,True
80,biker,cyclist,True
95,motorbiker,motorcyclist,True
97,oren,orange,True
104,planet-oat-original,oat milk carton,True
107,raddish,radish,True


In [9]:
# ============================================================
# Step 5.5 — Metric checks
# ============================================================

ev = evaluation_mod
metric_checks = {}

# ---- (a) Hand-computed toy case
toy = [
    {"image_id": "a", "domain": "D", "categories": {"x": {"count": 2}},
     "pred_counts": {"x": 3, "y": 1}, "query_classes": ["x", "y"]},
    {"image_id": "b", "domain": "D", "categories": {"x": {"count": 4}, "y": {"count": 1}},
     "pred_counts": {"x": 4}, "query_classes": ["x", "y"]},
]
_, _, tm = ev.evaluate_multi_label_counts(ev.build_multi_label_pairs(toy))
# x errors (1, 0) -> RMSE sqrt(0.5); y errors (1, -1) -> RMSE 1; y-nz: (-1) -> 1
expected = (np.sqrt(0.5) + 1.0) / 2
metric_checks["standard mRMSE (toy)"] = np.isclose(tm["mRMSE"], expected)
metric_checks["standard mRMSE-nz (toy)"] = np.isclose(tm["mRMSE_nz"], expected)
metric_checks["false positives counted (toy)"] = tm["false_positive_units"] == 1.0

_, om = ev.omnicount_reference_by_domain(toy)
# OmniCount code ignores the absent-class prediction y=1 in image a,
# and divides by the number of images (2).
metric_checks["OmniCount m_rmse (toy)"] = np.isclose(om["pooled_m_rmse"], (np.sqrt(0.5) + np.sqrt(0.5)) / 2)
metric_checks["OmniCount m_rmse_nz (toy)"] = np.isclose(om["pooled_m_rmse_nz"], (np.sqrt(0.5) + 1.0) / 2)

# ---- (b) FSC-147 regression: single-label metrics unchanged
s2 = pd.read_csv(B3R_S2_DIR / "B3R_s2_SG_v1_per_image.csv")
for name, col, exp in [("B0", "B0_count", 80.69), ("S", "S_count", 72.00), ("SG_v1", "SG_count", 61.93)]:
    res = [{"image_id": r.image_id, "categories": {r.category: {"count": r.gt_count}},
            "pred_count": getattr(r, col)} for r in s2.itertuples()]
    _, m = ev.evaluate_single_label_counts(res)
    metric_checks[f"FSC {name} MAE = {exp}"] = abs(m["mae"] - exp) < 0.005
    print(f"FSC dev100 {name:<6}: MAE {m['mae']:.2f}  RMSE {m['rmse']:.2f}  NAE {m['nae']:.3f}")

print("\nMetric checks:")
for k, ok in metric_checks.items():
    print(f"  {k:<34}: {'PASS' if ok else 'FAIL'}")
METRICS_PASS = all(metric_checks.values())

# ---- (c) Protocol comparison on OmniCount VAL GT (illustration, no model)
# Two trivial predictors: "predict GT" (perfect) and "predict 1 for every
# vocabulary class" (many false positives on absent classes).
val_ds = datasets_mod.OmniCount191Dataset(OMNICOUNT_ROOT, split="val", load_images=False)
val_results_perfect, val_results_ones = [], []
for i in range(len(val_ds)):
    s = val_ds[i]
    base = {"image_id": s["image_id"], "domain": s["domain"],
            "categories": s["categories"], "query_classes": s["domain_vocabulary"]}
    val_results_perfect.append({**base, "pred_counts": {c: v["count"] for c, v in s["categories"].items()}})
    val_results_ones.append({**base, "pred_counts": {c: 1 for c in s["domain_vocabulary"]}})

rows = []
for label, res in [("perfect", val_results_perfect), ("predict-1-everywhere", val_results_ones)]:
    _, _, sm = ev.evaluate_multi_label_counts(ev.build_multi_label_pairs(res))
    _, om = ev.omnicount_reference_by_domain(res)
    rows.append({"predictor": label,
                 "standard mRMSE": sm["mRMSE"], "standard mRMSE-nz": sm["mRMSE_nz"],
                 "OmniCount-code m_rmse (mean over domains)": om["mean_over_domains_m_rmse"],
                 "OmniCount-code m_rmse_nz (mean over domains)": om["mean_over_domains_m_rmse_nz"]})
protocol_df = pd.DataFrame(rows)
print("\nProtocol comparison on OmniCount val GT (no model):")
display(protocol_df.round(4))

FSC dev100 B0    : MAE 80.69  RMSE 270.23  NAE 0.559
FSC dev100 S     : MAE 72.00  RMSE 262.24  NAE 0.428
FSC dev100 SG_v1 : MAE 61.93  RMSE 246.59  NAE 0.445

Metric checks:
  standard mRMSE (toy)              : PASS
  standard mRMSE-nz (toy)           : PASS
  false positives counted (toy)     : PASS
  OmniCount m_rmse (toy)            : PASS
  OmniCount m_rmse_nz (toy)         : PASS
  FSC B0 MAE = 80.69                : PASS
  FSC S MAE = 72.0                  : PASS
  FSC SG_v1 MAE = 61.93             : PASS

Protocol comparison on OmniCount val GT (no model):


,predictor,standard mRMSE,standard mRMSE-nz,OmniCount-code m_rmse (mean over domains),OmniCount-code m_rmse_nz (mean over domains)
0,perfect,0.0000,0.0000,0.0000,0.0000
1,predict-1-everywhere,1.5932,3.4164,1.4721,1.5718


In [10]:
# ============================================================
# Step 5.6 — Save and Section 5 verdict
# ============================================================

split_df.to_csv(B3R_S5_DIR / "B3R_s5_omnicount_split_sizes.csv", index=False)
class_df.to_csv(B3R_S5_DIR / "B3R_s5_omnicount_classes_val_test.csv", index=False)
issues_df.to_csv(B3R_S5_DIR / "B3R_s5_omnicount_issues.csv", index=False)
overlap_df.to_csv(B3R_S5_DIR / "B3R_s5_omnicount_split_overlap.csv", index=False)
content_df.to_csv(B3R_S5_DIR / "B3R_s5_omnicount_val_test_content.csv", index=False)
prompt_df.to_csv(B3R_S5_DIR / "B3R_s5_omnicount_prompt_names.csv", index=False)
protocol_df.to_csv(B3R_S5_DIR / "B3R_s5_protocol_comparison_val.csv", index=False)

with open(B3R_S5_DIR / "B3R_s5_metadata.json", "w") as f:
    json.dump({
        "section": "B3R Section 5 — dataset and metric fixes",
        "date_utc": datetime.now(timezone.utc).isoformat(timespec="seconds"),
        "repo_commit": REPO_COMMIT,
        "omnicount_test_images_download": test_total,
        "omnicount_test_images_paper": PAPER_TEST_IMAGES,
        "omnicount_val_images_download": val_total,
        "leaky_val_domains": LEAKY_VAL_DOMAINS,
        "issues": issues_df.to_dict("records"),
        "loader_pass": LOADER_PASS,
        "metric_checks": {k: bool(v) for k, v in metric_checks.items()},
        "models_run": False,
        "test_predictions_used": False,
    }, f, indent=2)

all_pass = LOADER_PASS and METRICS_PASS
print("=" * 80)
print("B3R SECTION 5 — DATASET AND METRIC FIXES")
print("=" * 80)
print(f"Loader checks              : {'PASS' if LOADER_PASS else 'FAIL'}")
print(f"Metric checks              : {'PASS' if METRICS_PASS else 'FAIL'}")
print(f"OmniCount test (download)  : {test_total} images  (paper: {PAPER_TEST_IMAGES})")
print(f"Val domains overlapping test: {LEAKY_VAL_DOMAINS or 'none'}")
print(f"Dataset issues logged      : {len(issues_df)}")
print("\nVERDICT:", "PASS — loaders and metrics ready; review audit findings above"
      if all_pass else "FAIL — inspect the failing checks")

B3R SECTION 5 — DATASET AND METRIC FIXES
Loader checks              : PASS
Metric checks              : PASS
OmniCount test (download)  : 1957 images  (paper: 3252)
Val domains overlapping test: ['Fruits', 'Supermarket', 'Wild']
Dataset issues logged      : 3

VERDICT: PASS — loaders and metrics ready; review audit findings above


## Section 5 conclusion — dataset and metric fixes

**Loaders and metrics:** all checks pass. OmniCount points = box centres; per-domain query vocabularies exclude Roboflow placeholder classes (verified to have no annotations); duplicated `planet-oat-original` merged by name. FSC single-label metrics unchanged (dev100 B0/S/SG MAE 80.69 / 72.00 / 61.93); NAE added (0.559 / 0.428 / 0.445).

**OmniCount-191 audit:**
- Test split: 1,957 images (paper: 3,252); Household and Vegetables have no test split; 23 of 121 test-vocabulary classes have no test boxes.
- Source-image overlap (Roboflow exports): val–test 45 Fruits, 15 Supermarket, 2 Wild. These 62 val images are excluded from multi-label development. Train–test overlap does not affect this training-free pipeline but may favour trained competitors.
- OmniCount's released metric code ignores false positives on absent classes and normalises by image count; the standard (Chattopadhyay) protocol is therefore the primary metric. On val GT, a predict-1 baseline gives standard mRMSE-nz 3.42 vs OmniCount-code 1.57.

**Decisions:**
1. Primary OmniCount-191 metrics: standard mRMSE / mRMSE-nz on the downloaded test split; OmniCount-code values reported as secondary, flagged as not directly comparable.
2. Paper-reported OmniCount-191 numbers are not comparable (different test split and metric); at least one competitor (OmniCount) should be re-run on the same split if time allows.
3. Multi-label development uses OmniCount val minus the 62 test-overlapping images.

# 6. Held-out FSC-147 validation caching (GPU, resumable)

## Purpose

Generate model outputs for the **1,186 FSC-147 validation images not in dev100**, in the frozen cache formats, for B4 (held-out validation) and the guided pipeline (GPV):

- SAN target/background maps → A3c masks
- SAM2 AMG → B0 masks
- Marigold → depth

## Rules

- **No GT is loaded** and **no counting or evaluation** happens here; that is B4.
- Same models, settings and environment as Section 3 (current environment, Option A).
- **Resumable:** each finished image gets a "done" marker; re-running continues where it stopped.

## Not cached (cheap to regenerate later)

SAN D6 intermediate features and SAM2 prompt embeddings. SAN runs at ~0.15 s/image, so these can be produced on demand.

## Run order (fresh session, T4)

Section 1 → Steps 3.1, 3.2, 3.3, 3.3b, 3.4, 3.6 → Steps 6.1, 6.2, 6.3

Skip Sections 2, 4 and Steps 3.7–3.10. Expected time: ~2 hours.

In [ ]:
# ============================================================
# Step 6.1 — Define the held-out FSC-147 validation subset
# ============================================================
#
# Held-out = FSC-147 validation images NOT in dev100 (1,286 - 100).
# Only identifiers and class names are stored here: GT counts are
# NOT loaded, so caching is blind to the evaluation targets.
# ============================================================

import json
import time
from datetime import datetime, timezone

import pandas as pd

from src.datasets import FSC147Dataset

FSC147_RAW = PROJECT_ROOT / "datasets" / "FSC147" / "raw"
val_dataset = FSC147Dataset(root=FSC147_RAW, split="val", load_images=False)
assert len(val_dataset) == 1286, len(val_dataset)

# dev100 dataset_index must point at the same image in the val split
for row in dev100_df.itertuples(index=False):
    assert val_dataset.image_ids[row.dataset_index] == row.image_id, row

dev100_indices = set(dev100_df["dataset_index"].astype(int))

heldout_rows = []
for idx, image_id in enumerate(val_dataset.image_ids):
    if idx in dev100_indices:
        continue
    heldout_rows.append({
        "dataset_index": idx,
        "image_id": image_id,
        "category": val_dataset.image_to_class[image_id],
    })

heldout_df = pd.DataFrame(heldout_rows)
assert len(heldout_df) == 1186, len(heldout_df)
assert heldout_df["dataset_index"].is_unique
assert heldout_df["image_id"].is_unique
assert not set(heldout_df["dataset_index"]) & dev100_indices

missing_images = [
    r.image_id for r in heldout_df.itertuples(index=False)
    if not (FSC147_IMAGE_DIR / r.image_id).exists()
]
assert not missing_images, f"Missing images: {missing_images[:5]}"

# ---- Cache location shared by B4 and GPV
HELDOUT_CACHE_ROOT = PROJECT_ROOT / "cache" / "FSC147_val_heldout_1186"
HELDOUT_CACHE_DIRS = {
    "b0_masks": HELDOUT_CACHE_ROOT / "b0_masks",
    "a3c_masks": HELDOUT_CACHE_ROOT / "a3c_masks",
    "depth": HELDOUT_CACHE_ROOT / "depth",
    "m1_split_labels": HELDOUT_CACHE_ROOT / "m1_split_labels",  # not produced
}
HELDOUT_SAN_DIR = HELDOUT_CACHE_ROOT / "san"
HELDOUT_DONE_DIR = HELDOUT_CACHE_ROOT / "_done"
for d in [*HELDOUT_CACHE_DIRS.values(), HELDOUT_SAN_DIR, HELDOUT_DONE_DIR]:
    if d.name != "m1_split_labels":
        d.mkdir(parents=True, exist_ok=True)

HELDOUT_SUBSET_CSV = HELDOUT_CACHE_ROOT / "FSC147_val_heldout_1186.csv"
heldout_df.to_csv(HELDOUT_SUBSET_CSV, index=False)

print("FSC-147 val images      :", len(val_dataset))
print("dev100 (excluded)       :", len(dev100_indices))
print("Held-out images         :", len(heldout_df))
print("Held-out categories     :", heldout_df["category"].nunique())
print("Images on disk          : all present")
print("GT loaded               : NO")
print("Cache root              :", HELDOUT_CACHE_ROOT)

FSC-147 val images      : 1286
dev100 (excluded)       : 100
Held-out images         : 1186
Held-out categories     : 29
Images on disk          : all present
GT loaded               : NO
Cache root              : /content/drive/MyDrive/MSc_Project_ZeroShot_Counting/cache/FSC147_val_heldout_1186


In [ ]:
# ============================================================
# Step 6.2 — Resumable per-image caching (SAN/A3c, B0, depth)
# ============================================================
#
# For each held-out image, using the models built in Step 3.6:
#   SAN -> target/background maps -> A3c (90th percentile)
#   SAM2 AMG -> B0 masks
#   Marigold -> depth
# saved in the frozen cache formats, then a small "done" marker.
#
# RESUMABLE: images with a done marker are skipped. If the session
# disconnects, re-run Section 1, Steps 3.1-3.4 and 3.6, Step 6.1,
# then this cell — it continues where it stopped.
#
# No counting, no GT, no evaluation here (that is B4).
# ============================================================

import traceback

import numpy as np
import torch
from PIL import Image
from tqdm.auto import tqdm

for name in ["san_model", "amg", "marigold"]:
    assert name in globals(), f"{name} missing — run Step 3.6 first."


def done_marker_path(dataset_index, image_id):
    return HELDOUT_DONE_DIR / f"{int(dataset_index):05d}_{io_cache.image_stem(image_id)}.json"


def cache_one_image(row):
    image_path = FSC147_IMAGE_DIR / row.image_id
    paths = io_cache.cache_paths(row.dataset_index, row.image_id,
                                 cache_dirs=HELDOUT_CACHE_DIRS)
    san_path = HELDOUT_SAN_DIR / io_cache.san_scores_filename(row.image_id)
    t = {}

    image_pil = Image.open(image_path).convert("RGB")   # as ABC / M1
    image_rgb = b0.load_image_rgb_cv2(image_path)       # as B2
    width, height = image_pil.size

    t0 = time.time()
    target, background = semantic.run_san(san_model, image_pil, row.category, DEVICE)
    a3c, a3c_thr = semantic.a3c_mask(target)
    t["san_s"] = time.time() - t0

    t0 = time.time()
    b0_masks, b0_meta = b0.run_amg(amg, image_rgb)
    t["amg_s"] = time.time() - t0

    t0 = time.time()
    depth = depth_mod.run_marigold(marigold, image_pil, DEVICE)
    t["depth_s"] = time.time() - t0

    assert target.shape == a3c.shape == depth.shape == (height, width)
    assert b0_masks.shape[1:] == (height, width) or b0_masks.shape[0] == 0

    io_cache.save_san_scores(san_path, row.image_id, row.category, target, background)
    io_cache.save_a3c_mask(paths["a3c_masks"], a3c, a3c_thr, semantic.A3C_PERCENTILE,
                           row.dataset_index, row.image_id, row.category)
    io_cache.save_b0_masks(paths["b0_masks"], b0_masks, b0_meta)
    io_cache.save_depth(paths["depth"], depth)

    # Marker written LAST: its presence means all four files are complete.
    marker = {
        "dataset_index": int(row.dataset_index),
        "image_id": row.image_id,
        "category": row.category,
        "width": width,
        "height": height,
        "b0_num_masks": int(b0_masks.shape[0]),
        "a3c_threshold": float(a3c_thr),
        "a3c_foreground_fraction": float(a3c.mean()),
        "depth_min": float(depth.min()),
        "depth_max": float(depth.max()),
        **{k: round(v, 3) for k, v in t.items()},
        "date_utc": datetime.now(timezone.utc).isoformat(timespec="seconds"),
    }
    with open(done_marker_path(row.dataset_index, row.image_id), "w") as f:
        json.dump(marker, f)
    return marker


# ---- Resume: find what is already done
todo = [
    r for r in heldout_df.itertuples(index=False)
    if not done_marker_path(r.dataset_index, r.image_id).exists()
]
print(f"Already cached : {len(heldout_df) - len(todo)}")
print(f"To process     : {len(todo)}")

errors = []
t_start = time.time()
for i, row in enumerate(tqdm(todo, desc="Held-out caching")):
    try:
        cache_one_image(row)
    except Exception as e:
        errors.append({"dataset_index": int(row.dataset_index),
                       "image_id": row.image_id,
                       "error": repr(e),
                       "traceback": traceback.format_exc()[-2000:]})
        print(f"\nERROR {row.image_id}: {e!r}")
    if (i + 1) % 50 == 0:
        torch.cuda.empty_cache()

elapsed = time.time() - t_start
print(f"\nProcessed this run : {len(todo) - len(errors)}")
print(f"Errors             : {len(errors)}")
print(f"Elapsed            : {elapsed / 60:.1f} min")

if errors:
    pd.DataFrame(errors).to_csv(HELDOUT_CACHE_ROOT / "caching_errors.csv", index=False)
    print("Error details saved to caching_errors.csv — re-running this cell retries them.")

Already cached : 0
To process     : 1186


Held-out caching:   0%|          | 0/1186 [00:00<?, ?it/s]

Marigold predictions...:   0%|          | 0/1 [00:00<?, ?it/s]

Diffusion steps...:   0%|          | 0/4 [00:00<?, ?it/s]

Marigold predictions...:   0%|          | 0/1 [00:00<?, ?it/s]

...

Marigold predictions...:   0%|          | 0/1 [00:00<?, ?it/s]

Diffusion steps...:   0%|          | 0/4 [00:00<?, ?it/s]

Marigold predictions...:   0%|          | 0/1 [00:00<?, ?it/s]

Diffusion steps...:   0%|          | 0/4 [00:00<?, ?it/s]


Processed this run : 1186
Errors             : 0
Elapsed            : 127.7 min


In [ ]:
# ============================================================
# Step 6.3 — Validate the held-out cache and write the index
# ============================================================
#
# Re-opens EVERY cached file (catches truncated writes), checks
# shapes against the image size, and writes an index + metadata.
# ============================================================

index_rows, problems = [], []

for row in tqdm(heldout_df.itertuples(index=False), total=len(heldout_df),
                desc="Validating"):
    marker_path = done_marker_path(row.dataset_index, row.image_id)
    if not marker_path.exists():
        problems.append((row.image_id, "no done marker"))
        continue
    with open(marker_path) as f:
        marker = json.load(f)
    hw = (marker["height"], marker["width"])

    paths = io_cache.cache_paths(row.dataset_index, row.image_id,
                                 cache_dirs=HELDOUT_CACHE_DIRS)
    san_path = HELDOUT_SAN_DIR / io_cache.san_scores_filename(row.image_id)
    try:
        san = io_cache.load_san_scores(san_path)
        a3c, _ = io_cache.load_a3c_mask(paths["a3c_masks"])
        masks, meta = io_cache.load_b0_masks(paths["b0_masks"])
        depth = io_cache.load_depth(paths["depth"])

        assert san["target_score"].shape == hw, "SAN shape"
        assert san["target_category"] == row.category, "SAN category"
        assert a3c.shape == hw, "A3c shape"
        assert depth.shape == hw and np.isfinite(depth).all(), "depth"
        assert masks.shape[0] == marker["b0_num_masks"], "B0 count"
        assert masks.shape[0] == 0 or masks.shape[1:] == hw, "B0 shape"
    except Exception as e:
        problems.append((row.image_id, repr(e)))
        continue

    index_rows.append({
        **{k: marker[k] for k in ["dataset_index", "image_id", "category",
                                  "width", "height", "b0_num_masks",
                                  "a3c_threshold", "a3c_foreground_fraction",
                                  "depth_min", "depth_max",
                                  "san_s", "amg_s", "depth_s"]},
        "san_path": str(san_path),
        "a3c_path": str(paths["a3c_masks"]),
        "b0_path": str(paths["b0_masks"]),
        "depth_path": str(paths["depth"]),
    })

heldout_index_df = pd.DataFrame(index_rows).sort_values("dataset_index")
heldout_index_df.to_csv(HELDOUT_CACHE_ROOT / "heldout_cache_index.csv", index=False)

complete = len(heldout_index_df) == len(heldout_df) and not problems

with open(HELDOUT_CACHE_ROOT / "heldout_cache_metadata.json", "w") as f:
    json.dump({
        "purpose": "Held-out FSC-147 validation caches for B4 and GPV",
        "subset": "FSC-147 val minus dev100",
        "num_images_expected": len(heldout_df),
        "num_images_valid": len(heldout_index_df),
        "num_problems": len(problems),
        "complete": bool(complete),
        "contents": ["SAN target/background maps (.pt)", "A3c masks (90th pct)",
                     "B0 AMG masks (B2 format)", "Marigold depth (M1 format)"],
        "not_cached": ("SAN D6 intermediate features and SAM2 prompt "
                       "embeddings — cheap to regenerate when needed"),
        "repo_commit": REPO_COMMIT,
        "model_environment": MODEL_ENV,
        "gt_loaded": False,
        "test_set_accessed": False,
        "date_utc": datetime.now(timezone.utc).isoformat(timespec="seconds"),
    }, f, indent=2, default=str)

print("=" * 80)
print("B3R SECTION 6 — HELD-OUT CACHE")
print("=" * 80)
print(f"Valid cached images : {len(heldout_index_df)} / {len(heldout_df)}")
print(f"Problems            : {len(problems)}")
for p in problems[:10]:
    print("  ", p)
if len(heldout_index_df):
    print(f"\nMean time per image : SAN {heldout_index_df['san_s'].mean():.2f} s | "
          f"AMG {heldout_index_df['amg_s'].mean():.2f} s | "
          f"depth {heldout_index_df['depth_s'].mean():.2f} s")
    print(f"B0 masks per image  : median {heldout_index_df['b0_num_masks'].median():.0f}, "
          f"zero-mask images {int((heldout_index_df['b0_num_masks'] == 0).sum())}")
print("\nVERDICT:", "COMPLETE — held-out cache ready for B4"
      if complete else "INCOMPLETE — re-run Step 6.2 (it resumes), then 6.3")

Validating:   0%|          | 0/1186 [00:00<?, ?it/s]

B3R SECTION 6 — HELD-OUT CACHE
Valid cached images : 1186 / 1186
Problems            : 0

Mean time per image : SAN 0.09 s | AMG 4.55 s | depth 1.13 s
B0 masks per image  : median 17, zero-mask images 30

VERDICT: COMPLETE — held-out cache ready for B4
